![logo](../../logoline_c3s.svg)

# Reproducibility of drought indicators in the ERA5–Drought dataset

Production date: 2026-02-19.

Dataset version: 1.0.

Produced by: Enis Gerxhalija, Olivier Burggraaff (National Physical Laboratory).

## 🌍 Use case: Retrieving drought indicators from the ERA5–Drought dataset 

## ❓ Quality assessment question
* **Are the drought indicators in the ERA5–Drought dataset consistent with and reproducible from ERA5 data?**

Drought and wet periods have far-reaching environmental, societal, and economic impacts.
In the United Kingdom, the record-breaking hot and dry spring and summer of 2025 caused harvest losses worth more than £800 million [[ECIU+25](https://eciu.net/analysis/reports/2025/estimated-financial-losses-faced-by-uk-farmers-due-dry-weather-impacts-on-key-arable-crops)].
An 18-month drought in Brazil in 2023–24,
the most severe since monitoring began in 1954,
led to 720 health centres in affected areas becoming non-operational [[UNICEF+24](https://reliefweb.int/node/4111326)].
Extreme rainfall killed hundreds of people and caused billions of € in damages in Spain in 2024 [[Franch-Pardo+25](https://doi.org/10.48088/ejg.i.fra.16.2.286.297)].
Climate change is thought to be the primary driver behind the increase in drought and wet periods since the 1950s [[IPCC+23](https://doi.org/10.59327/IPCC/AR6-9789291691647)],
and this trend is expected to continue into the future.

Given these impacts,
monitoring drought and wet periods is vital.
Several quantitative proxies have been developed to aid in this monitoring,
generally based on
a combination of
total precipitation, soil moisture, evapotranspiration, and surface (air) temperature.
Two widely-employed indices are the 
_Standardised Precipitation Index (SPI)_ [[McKee+93](https://climate.colostate.edu/pdfs/relationshipofdroughtfrequency.pdf)]
and
_Standardised Precipitation-Evapotranspiration Index (SPEI)_ [[Vicente-Serrano+10](https://doi.org/10.1175/2009JCLI2909.1)].
Both operate on the same principle,
namely quantifying the amount of precipitation
over a given time frame at a given location
relative to its historical climatology.
For example,
an SPI value of +1 corresponds to a precipitation that is 1 standard deviation above the mean,
for that site and time frame.
This probabilistic approach lends itself to statements on the occurrence rate of extreme events [[McKee+93](https://climate.colostate.edu/pdfs/relationshipofdroughtfrequency.pdf)].
SPEI expands on SPI by including not just gains from precipitation, but also losses due to evapotranspiration.
SPI and SPEI can be evaluated over different _accumulation periods_ to probe phenomena at different time scales [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y), [EDO+25](https://drought.emergency.copernicus.eu/data/factsheets/factsheet_spi.pdf)]:
* 1, 3 months: soil moisture, flow in smaller creeks.
* 6, 12 months: reservoir storage, stream flow.
* 24, 36, 48 months: reservoir and groundwater recharge.

Indicators like SPI and SPEI depend on reliable input data in the form of historical meteorological time series.
Weather stations can provide these data with high accuracy and precision for specific sites,
but their coverage is sparse and their data are not always interoperable.
Reanalyses,
which integrate observations and forecast modelling,
can provide similar data consistently with long-term global coverage.
For example, ECMWF's fifth-generation reanalysis _ERA5_ provides meteorological data on a global ~31 km grid
going back to 1940 [[Soci+24](https://doi.org/10.1002/qj.4803), [Hersbach+20](https://doi.org/10.1002/qj.3803)].

ECMWF
now provide SPI and SPEI indices derived from their fifth-generation reanalysis ERA5,
in the ERA5–Drought dataset [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)],
[available from the Climate Data Store (CDS)](https://doi.org/10.24381/9bea5e16).
This derived dataset can be a valuable resource for applications in many sectors,
since it can be used out of the box,
freeing users from the need to find and process the underpinning meteorological data themselves.
ERA5–Drought provides monthly SPI and SPEI for 7 different accumulation periods,
interpolated to a 0.25° × 0.25° grid.
It includes ERA5's deterministic reanalysis as well as 10 propagated members of the ERA5-EDA ensemble.
The latter can be used to quantify the uncertainty in SPI or SPEI resulting from uncertainty in the input data.
Moreover, ERA5–Drought provides multiple quality flags that can be used to filter data that do not meet the requirements for SPI or SPEI to be applicable.

This quality assessment tests the consistency of ERA5–Drought with the underpinning ERA5 data in terms of its reproducibility.
By manually reproducing SPI, SPEI, and the associated quality indicators from ERA5 data and comparing the results,
we assess whether ERA5–Drought can indeed be used as a more convenient alternative to ERA5 for monitoring drought and wet periods.
Furthermore,
any discrepancies found in the comparison can shed light on caveats in the use of ERA5–Drought specifically and drought indicators broadly,
such as the underlying assumptions.
This notebook provides code for reproducing SPI and SPEI from ERA5 data and can be a jumping-off point for further analysis by the reader.

## 📢 Quality assessment statement

```{admonition} These are the key outcomes of this assessment
:class: note
* Drought indicators (SPI and SPEI) and quality flags provided in the ERA5–Drought dataset (reanalysis and ensemble) are highly consistent with values calculated from the underpinning ERA5 dataset. The pre-calculated values in ERA5–Drought can be used confidently.
* For SPI, some differences between ERA5–Drought and the reproduced dataset occur in isolated spikes or in regions that are captured within the included quality flags. These do not affect real-world use cases, but highlight that quality flags should be applied before application of the data.
* For SPEI, ambiguity in the choice of statistical distribution used is the most likely cause for differences between ERA5–Drought and its reproduction. The same is true for the associated normality quality flag.
* Users of SPI and SPEI datasets, such as ERA5–Drought, should take note of the underlying assumptions and potential sources of difference between datasets. The quality flags in ERA5–Drought should be used to mask low-quality data.

## 📋 Methodology

This quality assessment tests the reproducibility of drought indices in the ERA5–Drought
([_Monthly drought indices from 1940 to present derived from ERA5 reanalysis_](https://doi.org/10.24381/9bea5e16))
dataset
from their origins in ERA5.

This notebook provides and runs through Python code for reproducing
the SPI and SPEI indicators
as well as
the associated quality flags
(probability of zero precipitation _p{sub}`0`_ and Shapiro–Wilk normality _α_)
from ERA5.
These reproduced values are then compared to the pre-made data in ERA5–Drought in two case studies,
namely
a full time-series comparison in one location
and
a geospatial comparison at one point in time.
Because the goal of this assessment is to test the reproducibility of ERA5–Drought,
rather than intercomparing two independent datasets,
comparisons will be made on both low- and high-quality data,
instead of masking and ignoring low-quality data.
When using the dataset in practice,
masking low-quality data _is_ recommended, as explained in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].

This notebook is set up so that the test sites and dates are easily customised,
so you can download it and apply it to your preferred domain.

The analysis and results are organised in the following steps, which are detailed in the sections below:

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup)**
 * Import all required libraries.
 * Define helper functions.

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup)**
 * Define scope of analysis (time, location).
 * Set up CDS downloads for ERA5 and ERA5–Drought.
 * Download land-sea mask.

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-spi)**
 * Download ERA5 precipitation data.
 * Compute SPI over different accumulation periods.
 * Download ERA5–Drought SPI and quality flags.
 * Compare ERA5–Drought and reproduced SPI (time series, geospatial).
 * Compare ERA5–Drought and reproduced quality flags.

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-spei)**
 * Download ERA5 precipitation and potential evaporation data.
 * Compute SPEI over different accumulation periods.
 * Download ERA5–Drought SPEI and quality flags.
 * Compare ERA5–Drought and reproduced SPEI (time series, geospatial).
 * Compare ERA5–Drought and reproduced quality flags.

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-ensemble)**
 * Download ERA5 precipitation data.
 * Compute SPI for different ERA5 ensemble members.
 * Download ERA5–Drought SPI ensemble.
 * Compare ERA5–Drought and reproduced SPI ensembles.

**[](indicator_derived-drought-historical-monthly_consistency_q01:section-conclusion)**

## 📈 Analysis and results

(indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup)=
### 1. Code setup
```{note}
This notebook uses [earthkit](https://github.com/ecmwf/earthkit) for downloading ([earthkit-data](https://github.com/ecmwf/earthkit-data)) and visualising ([earthkit-plots](https://github.com/ecmwf/earthkit-plots)) data. Because earthkit is in active development, some functionality may change after this notebook is published. If any part of the code stops functioning, please raise an issue on our GitHub repository so it can be fixed.
```

#### Import required libraries
In this section, we import all the relevant packages needed for running the notebook.

In [1]:
# Input / Output
from pathlib import Path
import earthkit.data as ekd

# General data handling
import numpy as np
import pandas as pd
import xarray as xr
from functools import partial
from itertools import batched

# Analysis
from dask.array import nanmedian, ravel
from scipy import stats
from sklearn.metrics import confusion_matrix

# Visualisation
import earthkit.plots as ekp
from earthkit.plots.styles import Style
from cartopy import crs as ccrs
from matplotlib import pyplot as plt
from matplotlib.colors import BoundaryNorm, ListedColormap
plt.rcParams["grid.linestyle"] = "--"
from tqdm import tqdm, trange  # Progress bars

# Visualisation in Jupyter book -- automatically ignored otherwise
try:
    from myst_nb import glue
except ImportError:
    glue = None

# Type hints
from typing import Any, Callable, Iterable, Optional
from pandas.io.formats.style import Styler as pdStyler
from scipy.stats import rv_continuous as Distribution
from earthkit.plots.geography.domains import Domain
AnyDomain = (Domain | str)

#### Helper functions
This section defines some functions and variables used in the following analysis, allowing code cells in later sections to be shorter and ensuring consistency.

##### Data downloading & (pre-)processing

The following functions handle downloading data in specific circumstances, e.g. a geographical or temporal subset:

In [2]:
# Geographical
def request_data_for_one_site(*, lat, lon, half_width=0.25):
    """ Return a CDS request for a bounding box around a point (lon, lat). """
    north, south = lat + half_width, lat - half_width
    east , west  = lon + half_width, lon - half_width
    box = [north, west, south, east]
    box = [round(x, 2) for x in box]  # Round all coordinates to 2 digits
    request_box = {"area": box}
    return request_box

# Handling CDS size limits
def batch_requests(main_request: dict, *, batch_key: str="year", n: int=20) -> list[dict]:
    """ Take a big request (e.g. ERA5–Drought for all years) and separate it into smaller ones (size `n`). """
    full_range = main_request[batch_key]  # e.g. [1940, 1941, ..., 2024]
    batched_range = batched(full_range, n)  # e.g. [1940, ..., 1959], [1960, ..., 1979], ...
    subrequests = [main_request | {batch_key: batch} for batch in batched_range]  # create corresponding CDS requests
    return subrequests

The following functions ensure consistency in dimensions, which have inconsistent names (e.g. `valid_time` vs. `time`) and definitions (e.g. longitude 0 to 360 or –180 to 180, ensemble members from 0–9 or 1–10) between ERA5 and ERA5–Drought:

In [3]:
# Constants
ENSEMBLE_DIMENSION = "realization"

def rename_era5_dimensions(data: xr.Dataset) -> xr.Dataset:
    """
    Rename dimensions
    from ERA5 (valid_time, latitude, longitude)
    to ERA5–Drought (time, lat, lon)
    format.
    """
    data = data.rename({"valid_time": "time",
                        "latitude": "lat",
                        "longitude": "lon",
                       })
    return data

def longitude_360_to_180(data: xr.Dataset, longitude_dimension: str="lon") -> xr.Dataset:
    """ Convert longitude from 0..360 to -180..180 format. """
    longitude_new = ((data[longitude_dimension] - 180) % 360) - 180
    data = data.assign_coords({longitude_dimension: longitude_new})
    data = data.sortby(longitude_dimension)#.squeeze()
    return data

def number_to_ensemble_dimension(data: xr.Dataset,
                                 old_ensemble_dimension: str="number", new_ensemble_dimension: str=ENSEMBLE_DIMENSION,
                                 increment: int=1) -> xr.Dataset:
    """ Convert from the ERA5 `number` (0–9) to ERA5–Drought `realization` (1–10) ensemble dimension. """
    data = data.assign_coords({new_ensemble_dimension: data[old_ensemble_dimension] + increment})
    data = data.swap_dims({old_ensemble_dimension: new_ensemble_dimension})
    return data

The following functions handle unit conversions, e.g. m to mm precipitation:

In [4]:
# Unit conversion
def convert_unit(dataset: xr.Dataset, key: str, conversion: Callable, new_unit: str) -> None:
    """ Convert the units of dataset[key] to new_unit using a conversion function (e.g. lambda x: x*1000 for m to mm), in-place. """
    # Metadata handling
    metadata_old = dataset[key].attrs
    metadata_new = metadata_old | {"units": new_unit}

    # Apply changes
    dataset[key] = conversion(dataset[key]).assign_attrs(**metadata_new)

    return dataset  # Redundant because modified in-place

convert_m2mm = partial(convert_unit, conversion=(lambda x: x*1000), new_unit="mm")  # meter -> millimeter

The following function handles the overall pre-processing of ERA5 data: renaming dimensions, converting units, and adjusting longitudes:

In [5]:
def preprocess_era5(data: xr.Dataset) -> xr.Dataset:
    """ Pre-process ERA5 data (precipitation and/or evapotranspiration) into the right format for analysis. """
    # Dimensions
    data = rename_era5_dimensions(data)
    data = longitude_360_to_180(data, "lon")  # Convert longitude from 0..360 to –180..180
    if "expver" in data.coords:
        data = data.drop_vars("expver")

    # Units
    for var in data.data_vars:  # Assume all data_vars need to be converted to mm
        data = convert_m2mm(data, var)  # Convert from m to mm

    # Re-chunk (if data are chunked) for speed gain in fitting
    if data.chunks:
        data = data.chunk({"time": -1, "lat": 103, "lon": 360,})

    return data

The following function calculates the water balance `wb` from the total precipitation and potential evaporation ([](indicator_derived-drought-historical-monthly_consistency_q01:section-spei)):

In [6]:
def calculate_waterbalance(data: xr.Dataset, *,
                           precipitation_variable: str="tp", evaporation_variable: str="pev",
                           waterbalance_variable: str="wb") -> xr.Dataset:
    """
    Calculate the water balance from precipitation and evaporation.
    Assumes the ECMWF sign convention where downward flux is positive and upward flux is negative,
    i.e. WB = TP + PEV.
    """
    # Calculate water balance
    waterbalance = data[precipitation_variable] + data[evaporation_variable]

    # Apply variable name, metadata, and convert to dataset
    waterbalance = waterbalance.rename(waterbalance_variable)
    waterbalance = waterbalance.assign_attrs({"units": data[precipitation_variable].units,
                                              "long_name": "Water balance",
                                             })
    waterbalance = waterbalance.to_dataset()
    
    return waterbalance

The following functions aid in processing quality flag data from ERA5–Drought into a standard format:

In [7]:
def preprocess_era5drought_qualityflag(data: dict[Any, ekd.FieldList], variable_out: Optional[str]=None, *,
                                       month_dimension: str="month", time_dimension: str="time") -> xr.Dataset:
    """ 
    Turn a dict of earthkit FieldLists with ERA5–Drought quality flags, organised by accumulation period, into one big xr.Dataset.
    Rename the variables according to the dict keys; optionally using `variable_out` (e.g. SPEI -> SPEI1, SPEI3, etc).
    Convert a 12-month time dimension (2020-01-01, 2020-02-01, ...) into a month dimension (1, 2, ...).
    """
    # Convert field lists to xarray Datasets
    data = {key: ds.to_xarray(compat="equals")
            for key, ds in data.items()}

    # Rename variables to include keys (e.g. accumulation periods)
    first_fieldlist = next(iter(data.values()))
    data_var = next(iter(first_fieldlist.data_vars))
    if not variable_out:  # If not manually specified, append keys to existing variable name
        variable_out = data_var
    
    data = [ds.rename_vars({data_var: f"{variable_out}{key}"})
            for key, ds in data.items()]

    # Merge into one
    data = xr.merge(data, compat="equals")

    # Change time dimension to months
    data = data.assign_coords({month_dimension: data[time_dimension].dt.month})
    data = data.swap_dims({time_dimension: month_dimension})
    data = data.drop_vars(time_dimension)
    
    return data

##### Accumulation periods
The following cells contain constants and functions used in accumulating variables (e.g. precipitation) over time:

In [8]:
# Define constants such as the accumulation periods to use
ACCUMULATION_PERIODS = [1, 3, 6, 12, 24, 36, 48]  # Months
MONTHS = range(1, 13)  # January to December (inclusive)
MONTHS_NAMED = {
     1:  "January", 2:  "February", 3:  "March",
     4:  "April",   5:  "May",      6:  "June",
     7:  "July",    8:  "August",   9:  "September",
    10: "October", 11: "November", 12:  "December",
}
INDEXES_NAMED = {f"{index}{period}": f"{index}-{period}"  # Mapping from e.g. SPI1 to SPI-1
                 for index in ["SPI", "SPEI"]             # ERA5–Drought provides data in former format (SPI1)
                 for period in ACCUMULATION_PERIODS       # But figures should be labelled in the latter (SPI-1)
}

# Perform accumulation
def accumulate(data: xr.Dataset, var: str, *,
               accumulation_periods: Iterable[int]=ACCUMULATION_PERIODS, time_dimension: str="time") -> xr.Dataset:
    """
    Accumulate the given variable `var` (e.g. total precipitation) over different accumulation periods.
    """
    # Find the number of days in each month
    time_index = pd.to_datetime(data[time_dimension])  # Convert time dimension to datetime format
    days_in_month = xr.DataArray(time_index.days_in_month, coords={time_dimension: data[time_dimension]})  # Aligned with `data` coordinates

    # Monthly mean `var` → Monthly total `var`
    monthly_total = data[var] * days_in_month

    ## Accumulate over periods (rolling windows)
    result = data.copy()
    for period in accumulation_periods:
        rolling_sum = monthly_total.rolling({time_dimension: period}, center=False).sum()  # Rolling sum
        result[f"{var}{period}"] = rolling_sum  # Assign variable in same format as ERA5–Drought (e.g. SPI6)

    # Reorganise
    result = result.drop_vars([var])  # Drop original var
    if result.chunks:
        result = result.chunk(data.chunksizes)  # Rechunk like input data, if chunked

    return result

The following functions calculate the probability
(regular and accounting for the centre of mass)
of months with zero (accumulated) precipitation:

In [9]:
def number_of_months_with_zero_precipitation(data: xr.Dataset, *,
                                             round_to: int=2, threshold: float=0.,
                                             time_dimension: str="time") -> xr.Dataset:
    """
    Find the number of months with zero precipitation (and total months) in a given dataset.
    Rounds to `round_to` decimals (default 2, e.g. 0.01 mm).
    Zero precipitation means <= `threshold` (0. by default).
    Applied per calendar month and to all variables (e.g. accumulation periods).
    """
    # Round data, to 2 decimals by default
    data = data.round(round_to)

    # Find months below threshold
    is_zero = (data <= threshold)

    # Group by calendar month and find total number
    data_by_calendar_month = is_zero.groupby(is_zero[time_dimension].dt.month)
    n_zero  = data_by_calendar_month.sum(dim=time_dimension).astype(np.uint8)
    n_total = data_by_calendar_month.count(dim=time_dimension).astype(np.uint8)

    return n_total, n_zero

def probability_of_zero_precipitation(data: xr.Dataset, **kwargs) -> xr.Dataset:
    """ Calculate the simple probability of zero precipitation in the given dataset, per calendar month. """
    # Find number of months (total / zero precipitation)
    n_total, n_zero = number_of_months_with_zero_precipitation(data, **kwargs)

    # Calculate simple probability
    p_zero = n_zero / (n_total + 1)

    return p_zero
   
def probability_of_zero_precipitation_weighted(data: xr.Dataset, **kwargs) -> xr.Dataset:
    """ Calculate the weighted probability of zero precipitation in the given dataset, per calendar month. """
    # Find number of months (total / zero precipitation)
    n_total, n_zero = number_of_months_with_zero_precipitation(data, **kwargs)    

    # Calculate weighted probability
    p_zero = xr.where(
        n_zero > 0,                          # Condition: More than 0 months with zero precipitation
        (n_zero + 1) / (2 * (n_total + 1)),  # If condition met: weighted probability
        0                                    # If condition not met: just 0
    )

    return p_zero

##### Calculating SPI and SPEI
The following functions fit the appropriate distributions
(gamma, generalised logistic)
and calculate corresponding CDF and SPI / SPEI values:

In [10]:
# General fitting function
def fit_distributions(reference_data: xr.Dataset, distribution: Distribution, *,
                      time_dimension: str="time") -> xr.Dataset:
    """
    Fit distributions (e.g. gamma) for each month and accumulation period using xarray parallelisation.
    Data are assumed to have been sliced to the reference period.
    """
    # Define fitting function for the given distribution
    def fit(y):
        y = y[np.isfinite(y)]
        try:
            params = distribution.fit(y)
        except:  # If fitting fails, return NaN
            # Should only catch a specific Exception type
            params = [np.nan]*(distribution.numargs+2)
        finally:  # Always convert result (values or NaN) to desired format
            params = np.stack(params, axis=-1)  # Extend with axis for stats (alpha, loc, scale, ...)
        return params

    # Split dataset by month
    reference_data_by_month = reference_data.groupby(reference_data[time_dimension].dt.month)

    # Apply fitting function by month
    params = xr.apply_ufunc(fit, reference_data_by_month,
                            input_core_dims=[[time_dimension]], output_core_dims=[["stat"]],
                            vectorize=True, dask="parallelized",
                            dask_gufunc_kwargs={"output_sizes": {"stat": distribution.numargs+2}},  # e.g. 3 for gamma (alpha, loc, scale)
                            output_dtypes=[np.float64],
                           )

    # Re-chunk (if data are chunked) for speed gain
    if reference_data.chunks:
        params = params.chunk({"month": -1})

    return params

# Fitting functions for SPI, SPEI distributions specifically
fit_monthly_spi  = partial(fit_distributions, distribution=stats.gamma)
fit_monthly_spei = partial(fit_distributions, distribution=stats.genlogistic)

The following functions apply the fitted distributions to calculate CDF values for observed data:

In [11]:
# Helper function: Clip the CDF to avoid infinities
def clip_cdf(cdf: xr.Dataset, threshold: float=1e-16) -> xr.Dataset:
    """ Clip CDF values to `threshold` on both sides. """
    cdf_clipped = cdf.clip(threshold, 1 - threshold)
    return cdf_clipped

# Main function: Compute CDF values for observed data
def compute_cdf(data: xr.Dataset, parameters: xr.Dataset, distribution: Distribution, *,
                month_dimension: str="month", time_dimension: str="time") -> xr.Dataset:
    """
    For observed `data`, compute the corresponding cumulative distribution function (CDF)
    values for the given `distribution` and `parameters`.

    Assumes that `data` and `parameters` have compatible:
        Coordinates (except time)
        Variables (e.g. corresponding to accumulation periods)
    """
    # Create a month dimension for broadcasting with the one in parameters
    data_month = data[time_dimension].dt.month.rename(month_dimension)

    # Extract parameters
    nr_parameters = parameters.sizes["stat"]  # 3 for gamma / genlogistic
    parameters_extracted = [parameters.sel(stat=j).sel({month_dimension: data_month}) for j in range(nr_parameters)]

    # Calculate CDF values by month
    cdf = xr.apply_ufunc(distribution.cdf, data, *parameters_extracted,
                         input_core_dims=[[], [], [], []], output_core_dims=[[]],
                         vectorize=True, dask="parallelized",
                         output_dtypes=[np.float64],
                         keep_attrs=True,
                        )
    cdf = clip_cdf(cdf)  # Clip extreme values to avoid infinities

    # Rechunk like input data, if chunked
    if data.chunks:
        cdf = cdf.chunk(data.chunksizes)

    return cdf

# Compute SPI, SPEI with preset distributions
compute_cdf_spi  = partial(compute_cdf, distribution=stats.gamma)
compute_cdf_spei = partial(compute_cdf, distribution=stats.genlogistic)

def adjust_cdf_for_zero_precipitation(cdf: xr.Dataset, data: xr.Dataset, *,
                                      time_dimension: str="time") -> xr.Dataset:
    """
    Adjust CDF for months with zero precipitation, following Stagge+15 (doi:10.1002/joc.4267) method.
    `cdf` can be for any time range, `data` should be for the reference period only.
    """ 
    # Calculate probability of zero precipitation
    p_zero = probability_of_zero_precipitation_weighted(data)

    # Rechunk for efficiency, if input data are chunked
    if cdf.chunks:
        p_zero = p_zero.chunk({"month": -1})  # Rechunk for efficiency

    # Adjust CDF by calendar month
    def adjust_cdf_by_calendar_month(cdf_one_month: xr.Dataset) -> xr.Dataset:
        this_month = cdf_one_month[time_dimension][0].month.values # Cannot use GroupBy label inside .map() unfortunately
        p_zero_this_month = p_zero.sel({"month": this_month})
        cdf_adjusted = p_zero_this_month + (1 - p_zero_this_month) * cdf_one_month
        return cdf_adjusted

    cdf_by_calendar_month = cdf.groupby(cdf[time_dimension].dt.month)
    cdf_adjusted = cdf_by_calendar_month.map(adjust_cdf_by_calendar_month)  
    # Alternative approach: Broadcast p_zero against cdf instead of using GroupBy (not implemented here)

    # Rechunk like input data, if chunked
    if cdf.chunks:
        cdf_adjusted = cdf_adjusted.chunk(cdf.chunksizes)

    return cdf_adjusted

The following functions calculate the SPI/SPEI index based on CDF values:

In [12]:
# Main function: Convert CDF values to indexes
def cdf_to_index(cdf: xr.Dataset, *, var: Optional[str]=None, index_name: Optional[str]=None) -> xr.Dataset:
    """ Transform CDF values to a standard normal distribution. """
    cdf = clip_cdf(cdf)  # Clip extreme values to avoid infinities

    # Convert CDF to index
    index_values = xr.apply_ufunc(stats.norm.ppf, cdf, 0.0, 1.0,  
                                  input_core_dims=[[], [], []], output_core_dims=[[]],
                                  vectorize=True, dask="parallelized",
                                  output_dtypes=[np.float64],
                                  keep_attrs=True,
                                 )

    # Adjust variable names to ERA5–Drought format (e.g. SPI6) if desired
    if var and index_name:
        rename_variables = {datavar: datavar.replace(var, index_name) for datavar in cdf.data_vars if var in datavar}
        index_values = index_values.rename_vars(rename_variables)

    return index_values

# Compute SPI, SPEI with preset names
cdf_to_spi  = partial(cdf_to_index, var="tp", index_name="SPI")
cdf_to_spei = partial(cdf_to_index, var="wb", index_name="SPEI")

For convenience, we also provide the following functions that wrap the entire process from data to SPI/SPEI into one:

In [13]:
# Full SPI pipeline
def calculate_spi_from_era5(data: xr.Dataset, *, reference_window: dict[str, slice],
                            do_preprocessing=False, evaluation_window: Optional[dict[str, slice]]=None,
                            precipitation_variable: str="tp",
                            accumulation_periods: Iterable[int]=ACCUMULATION_PERIODS,
                           ) -> xr.Dataset:
    """
    Calculate SPI from ERA5 precipitation data, including all steps.
    Input should be ERA5 data in xarray format, either
        freshly downloaded (`do_preprocessing=True`)
        or
        pre-processed (`do_preprocessing=False`).
    Some parameters can be adjusted,
        e.g. the name of the precipitation variable ("tp" by default).
        This should make the function easier to transfer to other datasets.
    """
    # Optional: pre-process to desired format
    if do_preprocessing:
        data = preprocess_era5(data)

    # Accumulate total precipitation
    data = accumulate(data, precipitation_variable, accumulation_periods=accumulation_periods)

    # Select data in reference window
    data_reference = data.sel(**reference_window)
    
    # Fit gamma distribution
    spi_parameters = fit_monthly_spi(data_reference)

    # Optional: Only calculate index in evaluation window
    if evaluation_window:
        data = data.sel(**evaluation_window)

    # Compute CDF time series
    cdf = compute_cdf_spi(data, spi_parameters)

    # Adjust CDF
    cdf_adjusted = adjust_cdf_for_zero_precipitation(cdf, data_reference)

    # Calculate SPI from adjusted CDF
    spi = cdf_to_spi(cdf_adjusted)

    # Rechunk like input data, if chunked
    if spi.chunks:
        spi = spi.chunk(data.chunksizes)

    return spi

# Full SPEI pipeline
def calculate_spei_from_era5(data: xr.Dataset, *, reference_window: dict[str, slice],
                             do_preprocessing=False, evaluation_window: Optional[dict[str, slice]]=None,
                             precipitation_variable: str="tp", evaporation_variable: str="pev",
                             accumulation_periods: Iterable[int]=ACCUMULATION_PERIODS,
                            ) -> xr.Dataset:
    """
    Calculate SPEI from ERA5 precipitation and potential evaporation data, including all steps.
    Input should be ERA5 data in xarray format, either
        freshly downloaded (`do_preprocessing=True`)
        or
        pre-processed (`do_preprocessing=False`).
    Some parameters can be adjusted,
        e.g. the name of the precipitation variable ("tp" by default).
        This should make the function easier to transfer to other datasets.
    """
    # Optional: pre-process to desired format
    if do_preprocessing:
        data = preprocess_era5(data)

    # Calculate water balance
    data = calculate_waterbalance(data)

    # Accumulate water balance
    data = accumulate(data, "wb")

    # Select data in reference window
    data_reference = data.sel(**reference_window)

    # Fit generalised logistic distribution
    spei_parameters = fit_monthly_spei(data_reference)

    # Optional: Only calculate index in evaluation window
    if evaluation_window:
        data = data.sel(**evaluation_window)

    # Compute CDF time series
    cdf = compute_cdf_spei(data, spei_parameters)

    # Calculate SPI from CDF
    spei = cdf_to_spei(cdf)

    # Rechunk like input data, if chunked
    if spei.chunks:
        spei = spei.chunk(data.chunksizes)

    return spei

##### Categorising SPI and SPEI
The following cell defines categories for SPI and SPEI values, e.g. "severe drought":

In [14]:
# Category format: [lower limit, upper limit, label, colour]
# Colours are picked from Fig. 4 in Keune+25 and labelled for convenience
# Limits are left-inclusive: [lower, upper)
# Extreme values of 100 / -100 should be treated as infinities but play nicer with some code than np.inf

CATEGORIES_SPI = [  # Approximates the GDO scheme
    (   2.00, 100,     "Extremely wet",            "#7a007b"),  # deepest purple 
    (   1.50,   2.00,  "Severely wet",             "#af51c3"),  # dark purple
    (   1.00,   1.50,  "Moderately wet",           "#eaccf8"),  # medium purple
    (   0.00,   1.00,  "Near‑normal / mildly wet", "#ffffff"),  # white
    (  -1.00,   0.00,  "Near‑normal / mildly dry", "#ffffff"),  # white
    (  -1.50,  -1.00,  "Moderately dry",           "#fffc03"),  # yellow
    (  -2.00,  -1.50,  "Severely dry",             "#feaa00"),  # orange
    (-100,     -2.00,  "Extremely dry",            "#ff0100"),  # red
]

CATEGORIES_SPEI = [
    (   2.33, 100,    "Extremely wet",  "#01148b"),  # very dark navy
    (   1.65,   2.33, "Severely wet",   "#1871de"),  # strong blue
    (   1.28,   1.65, "Moderately wet", "#14acf4"),  # medium blue
    (   0.84,   1.28, "Mildly wet",     "#00f2fe"),  # cyan
    (  -0.84,   0.84, "Near-normal",    "#9afa93"),  # light green
    (  -1.28,  -0.84, "Mildly dry",     "#fdc403"),  # yellow
    (  -1.65,  -1.28, "Moderately dry", "#f2631d"),  # orange
    (  -2.33,  -1.65, "Severely dry",   "#df2929"),  # red
    (-100,     -2.33, "Extremely dry",  "#8c1b1a"),  # dark red
]

The following functions categorise SPI / SPEI values into said categories:

In [15]:
def _digitise_dataset(data: xr.Dataset, bin_edges: list[float], *, persist=True) -> xr.Dataset:
    """
    Digitise all variables in `data` according to a list of left bin edges, e.g. SPI categories ("extremely dry").
    In this notebook, do not call this function directly, but use the categorise_dataset wrapper.
    """
    # Perform digitisation
    data_digitised = xr.apply_ufunc(np.digitize, data,
                                    kwargs={"bins": bin_edges, "right": False}, 
                                    input_core_dims=[[]],
                                    vectorize=True, dask="parallelized",
                                    output_dtypes=[np.uint8],  # uint8 is small; not suitable for >256 categories
    )

    # Persist in memory if desired (default True because uint8s are small)
    if persist:
        data_digitised = data_digitised.persist()

    return data_digitised

def categorise_dataset(data: xr.Dataset, categories: Iterable[Iterable], **kwargs) -> xr.Dataset:
    """
    Categorise a dataset into bins defined by category thresholds.
    Extracts bin edges from `categories` and then digitises `data` accordingly.
    Handles NaNs by adding a dummy category (extremely high bin edge).
    """
    # Extract bin edges from categories
    # Last element is dropped to extend range to infinity (although values should be clipped anyway)
    bin_edges = [category[0] for category in categories[:-1]]

    # Add dummy category to catch NaNs
    bin_edges = [100000] + bin_edges

    # Apply digitisation
    data_categorised = _digitise_dataset(data, bin_edges, **kwargs)

    return data_categorised

##### Quality flags
The following functions create and apply quality flag tests, such as the probability of zero precipitation and the Shapiro–Wilk normality test:

In [16]:
def shapiro_wilk_normality(data: xr.Dataset, *,
                           time_dimension: str="time", month_dimension: str="month") -> xr.Dataset:
    """
    Calculate the Shapiro–Wilk normality p-value for every variable in `data`
        along the `time_dimension`, grouped by month.
    Make sure to provide data for the desired period (generally the reference window) only.
    """
    # Group by month
    data_by_month = data.groupby(data[time_dimension].dt.month)

    # Perform test
    _ , pval = xr.apply_ufunc(stats.shapiro, data_by_month,
                              input_core_dims=[[time_dimension]], output_core_dims=[[],[]],
                              vectorize=True, dask="parallelized",
                              output_dtypes=[np.float64, np.float64],
                              keep_attrs=True,
                             )
    return pval

def apply_sw_quality_mask(era5_quality: xr.Dataset, index_ds: xr.Dataset, indicator: str):
    """
    Apply significance-based quality masks to drought indicator datasets.
    """
    index_ds = safe_rename(index_ds)
    for period in ACCUMULATION_PERIODS:
        sig = era5_quality[f"significance_{period}"]
        sig = sig.assign_coords(time=sig.time.dt.month)
        mask = sig.sel(time=index_ds[f"{indicator}{period}"].time.dt.month)
        index_ds[f"{indicator}{period}"] = index_ds[f"{indicator}{period}"].where(mask.values == 1)
    return index_ds

##### Statistics
The following functions calculate and display the difference (by month) between datasets:

In [17]:
# Helper functions: Calculate statistics
def align_data_variables(data1: xr.Dataset, data2: xr.Dataset, var: Optional[str]="") -> tuple[xr.Dataset]:
    """
    Only look at variables that are in both datasets, following the order in `data2`.
    Optional: variables have to include `var`, e.g. "SPI".
    """
    matching_variables = [data_var for data_var in data2.data_vars
                          if data_var in data1.data_vars and var in data_var]
    data1, data2 = [data[matching_variables] for data in (data1, data2)]
    return data1, data2

def median_by_month(data: xr.Dataset, *, time_dimension: str="time") -> xr.Dataset:
    """ Calculate the median by month, flattening all other dimensions (time, lat, lon, etc.) """
    data_by_month = data.groupby(data[time_dimension].dt.month)
    median = data_by_month.quantile(0.5, dim=..., skipna=True)  # .quantile function has better dask support than .median
    median = median.drop_vars("quantile")  # Drop unneeded coordinate
    return median

def fraction_by_month(data: xr.Dataset, *, time_dimension: str="time", as_percentage=False) -> xr.Dataset:
    """ Given a dataset of bools, return the fraction per calendar month that are True. """
    data_by_month = data.groupby(data[time_dimension].dt.month)
    fraction = data_by_month.sum(dim=...) / data_by_month.count(dim=...)  # dim=... reduces over all dimensions (e.g. lat, lon)]
    fraction = fraction.drop_vars(var for var in fraction.coords if var != "month")  # Remove unneeded coordinates (e.g. lat, lon for 1D dataset)
    if as_percentage:
        fraction *= 100
    return fraction

# Main function: Calculate statistics
def comparison_monthly_statistics(data1: xr.Dataset, data2: xr.Dataset, *,
                                  threshold: float=0.10,
                                  time_dimension: str="time") -> pd.DataFrame:
    """
    Given two datasets, calculate a number of statistics for each variable and return the result in a table.
    """
    # Align data variables
    data1, data2 = align_data_variables(data1, data2)

    # Calculate difference
    difference = data2 - data1
    difference_absolute = xr.ufuncs.abs(difference)

    # Calculate monthly medians
    md  = median_by_month(difference,          time_dimension=time_dimension).to_pandas()
    mad = median_by_month(difference_absolute, time_dimension=time_dimension).to_pandas()

    # Calculate fraction over threshold
    difference_over_threshold = (difference_absolute >= threshold)
    fraction_over_threshold = fraction_by_month(difference_over_threshold, time_dimension=time_dimension, as_percentage=True).to_pandas()
    
    # Combine into one DataFrame
    stats = pd.concat({"MΔ": md,
                       "M|Δ|": mad,
                      f"|Δ| ≥ {threshold:.2f}": fraction_over_threshold}, axis=1)
    stats = stats.swaplevel(0, 1, axis=1)             # Accumulation period on top, statistic below
    stats = stats[data2.data_vars]                    # Same order as inputs

    return stats

In [18]:
# Helper function: Styling for statistics
def _add_matching_vertical_separators(styler: pdStyler, *,
                                      colour="#bbbbbb", width="1px") -> pdStyler:
    """
    Add vertical separators corresponding to the top level columns,
        e.g. SPI1 – SPI3 etc. but not Δ – |Δ| in comparison_monthly_statistics outputs.

    Note: This function is largely AI-generated, with manual edits.
      - Adds a left border to the first subcolumn of each top-level group
        in the BODY (data cells),
      - Adds the same border to the HEADER cells for both level 0 and level 1
        at the same positions (using .col{i} classes).
    """
    # Get data, check applicability
    df = styler.data
    if not isinstance(df.columns, pd.MultiIndex) or df.columns.nlevels < 2:
        raise ValueError("Expected MultiIndex columns with ≥2 levels.")

    # Group boundaries (indices of first subcolumn of each new top-level label)
    lvl0 = df.columns.get_level_values(0).to_numpy()
    breaks = np.flatnonzero(lvl0[1:] != lvl0[:-1]) + 1
    breaks = np.r_[0, breaks]  # Include first element

    # Define common styles
    border_left = f"{width} solid {colour}"

    # 1) BODY: draw the vertical rule down through the data
    for i in breaks:
        styler = styler.set_properties(
            subset=pd.IndexSlice[:, df.columns[i]],
            **{"border-left": border_left}
        )

    # 2) HEADER: mirror the exact same left border on header cells
    # Each header cell at position i has classes: th.col_heading.level{0|1}.col{i}
    header_rules = []
    for i in breaks:
        header_rules.extend([
            {"selector": f"th.col_heading.level0.col{i}",
             "props": [("border-left", border_left)]}
            ,
            {"selector": f"th.col_heading.level1.col{i}",
             "props": [("border-left", border_left)]}
        ])

    # Optional: normalize other header borders so only our verticals stand out
    header_rules.extend([
        {"selector": "th.col_heading", "props": [("border-bottom", "0")]},
        # keep overall layout tight and consistent
        {"selector": "table",
         "props": [("border-collapse", "separate"), ("border-spacing", "0")]}
    ])

    styler = styler.set_table_styles((styler.table_styles or []) + header_rules)

    return styler

# Main function: Display statistics
def display_monthly_statistics(comparison_stats: pd.DataFrame, *,
                               label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="") -> pdStyler:
    """
    Display the statistics calculated in comparison_monthly_statistics with more style.
    Note: does NOT do the actual calculations, unlike in other notebooks.
    """
    # Use words for month names + Format indexes for output (e.g. SPI1 to SPI-1)
    comparison_stats = comparison_stats.rename(index=MONTHS_NAMED).rename_axis(None, axis=0)
    comparison_stats = comparison_stats.rename(columns=INDEXES_NAMED)

    # Apply styles:
    # Number of digits
    # Caption
    # No sticky index – does not play nice with jupyter-book
    # Apply vertical lines to separate columns
    formatted = comparison_stats.style \
                                .format(precision=4)  \
                                .set_caption(f"{label2} – {label1}{title_suffix}")  \
                                .pipe(_add_matching_vertical_separators)
    
    # Center headers ; AI-generated
    formatted = formatted.set_table_styles(
        (formatted.table_styles or []) + [
            {'selector': 'th.col_heading',
             'props': [('text-align', 'center'),
                       ('vertical-align', 'bottom'),
                      ],
             },
        ]
    )

    return formatted

The following functions compare quality flags quantitatively:

In [19]:
def count_flagged_months(data: xr.Dataset, *, invert=True) -> xr.Dataset:
    """ For a dataset with quality flags for 12 months, return a new dataset with the number of months failing that flag. """
    sum_by_month = data.sum(dim="month").astype(np.uint8)  # Number of months *passing* the flag
    if invert:  # Make False for e.g. mismatched months
        sum_by_month = 12 - sum_by_month                   # Number of months *failing* the flag
    return sum_by_month


def _matching_fraction(data1: xr.Dataset, data2: xr.Dataset, *,
                       precision: int=3) -> pd.Series:
    # Round to precision if floating-point numbers
    if "float" in data1.dtypes.values():
        data1, data2 = [data.round(precision) for data in (data1, data2)]

    # Compare and determine matching fraction
    equal = (data1 == data2)
    equal_fraction = equal.sum() / equal.count()
    equal_fraction = equal_fraction * 100  # %

    # Tabulate
    equal_fraction = equal_fraction.compute()  # Perform calculations – this step may take a few minutes
    equal_fraction = equal_fraction.to_pandas()  # -> pd.Series

    return equal_fraction


def compare_quality_flags(flags: dict[str, Iterable[xr.Dataset]],  # e.g. p0 (probabilities), p0 < 0.33 (mask)
                          label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="") -> pdStyler:
    # Set up progress bar
    flags = tqdm(flags.items(), desc="Finding matching flags", leave=False, unit="pair")

    # Perform comparisons
    equal_fraction = {"Matching "+key: _matching_fraction(*data) for key, data in flags}  # str: pd.Series
    
    # Tabulate
    equal_fraction = pd.DataFrame(equal_fraction).T  # Flags as rows, variables as columns
    equal_fraction = equal_fraction.rename(columns=INDEXES_NAMED)  # e.g. SPI1 to SPI-1

    # Stylise
    equal_fraction = equal_fraction.style \
                                   .format(precision=2)  \
                                   .set_caption(f"{label1} vs. {label2}\nQuality flag matches{title_suffix}")

    return equal_fraction

##### Visualisation

The following cell defines [earthkit-plots styles](https://earthkit-plots.readthedocs.io/en/latest/examples/examples/introduction/05-styles.html) for the indicators.
These styles define the colour maps and colour bar ranges for each quantity.

In [20]:
# Helper function: Translate tabulated categories to Style
def categories_to_earthkit_style(var_categories: Iterable[Iterable]) -> dict:  # e.g. CATEGORIES_SPI
    """ From a list of categories, create an earthkit.plots Style. """
    colors = ListedColormap([category[3] for category in var_categories[::-1]])  # Colours in reverse (ascending) order
    levels = [category[0] for category in var_categories[-2::-1]]
    style  = {"colors": colors, "levels": levels, "extend": "both"}
    return style

# Styles for SPI, SPEI based on Keune+25 colours
_style_spi  = categories_to_earthkit_style(CATEGORIES_SPI)
_style_spei = categories_to_earthkit_style(CATEGORIES_SPEI)
_style_spi_diff = _style_spei_diff = {"colors": plt.cm.RdBu.resampled(11), "vmin": -1, "vmax": 1, "extend": "both", "normalize": False}

# Styles for quality flags
_style_probability = {"cmap": plt.cm.magma.resampled(30), "vmin": 0, "vmax": 1, "normalize": False}
_style_probability_diff = {"cmap": plt.cm.RdBu.resampled(15), "vmin": -1, "vmax": 1, "normalize": False}
_style_flag_summed = {"cmap": ListedColormap(["#000000", "#ffffcd", "#f4eabb", "#ebd4ac", "#e2bc99", "#d5a888", "#c8947a",
                                                         "#bf7e6b", "#b4685d", "#a7544e", "#9b3d3f", "#8d2733", "#800029",]),
                      "norm": BoundaryNorm(np.arange(-0.5, 13, 1), 13),
                      "ticks": np.arange(0, 13, 1),
                      "normalize": False,
                     }

# Individual styles
# Set up like this so they can still be edited individually
styles = {
    # Indexes
    "SPI":  Style(**_style_spi),  "SPI_diff":  Style(**_style_spi_diff),
    "SPEI": Style(**_style_spei), "SPEI_diff": Style(**_style_spei_diff),

    # Quality flags
    "probability": Style(**_style_probability), "probability_diff": Style(**_style_probability_diff),
    "flag_summed": Style(**_style_flag_summed),
}

The following cell contains some base helper functions (e.g. displaying in Jupyter Notebook or Jupyter Book style, adding textboxes with consistent formatting, etc.):

In [21]:
# Visualisation: Helper functions, general
def _glue_or_show(fig, glue_label=None):
    try:
        glue(glue_label, fig, display=False)
    except TypeError:
        plt.show()
    finally:
        plt.close()

def _add_textbox_to_subplots(text: str, *axs: plt.Axes | ekp.Subplot, right=False) -> None:
    """ Add a text box to each of the specified subplots. """
    # Get the plt.Axes for each ekp.Subplot
    axs = [subplot.ax if isinstance(subplot, ekp.Subplot) else subplot for subplot in axs]

    # Set up location
    x = 0.95 if right else 0.05
    horizontalalignment = "right" if right else "left"

    # Add the text
    for ax in axs:
        ax.text(x, 0.95, text, transform=ax.transAxes,
        horizontalalignment=horizontalalignment, verticalalignment="top",
        bbox={"facecolor": "white", "edgecolor": "black", "boxstyle": "round",
              "alpha": 1})

def plot_zero_line(*axs: plt.Axes) -> None:
    """ Plot the y=0 line with consistent styling. """
    for ax in axs:
        ax.axhline(0, color="black", zorder=1.9)

The following functions are also base helper functions, but specific to geospatial plots.
Administrative boundaries are downloaded from
the _Geographic Information System of the Commission_ (GISCO)
through earthkit-plots,
and are © EuroGeographics.

In [22]:
# Default geospatial domain
# To do: Use Robinson CRS but maintain aspect ratio
DOMAIN_GLOBAL = Domain.from_string("global")
# DOMAIN_GLOBAL = Domain.from_string("global", crs=ccrs.Robinson())

# Visualisation: Helper functions for geospatial plots
def decorate_fig(fig: ekp.Figure, *, title: Optional[str]="") -> None:
    """ Decorate an earthkit figure with land, coastlines, etc. """
    fig.land()
    fig.borders(source="gisco")
    fig.coastlines(color="black")
    fig.gridlines(linestyle=plt.rcParams["grid.linestyle"])
    fig.title(title)

The following functions handle visualisation of accumulated variables such as total precipitation and water balance:

In [23]:
# Main function: Plot any accumulated variable
def plot_accumulated_variable(data: xr.Dataset, site: dict[str, slice], var: str, *,
                              accumulation_periods: Iterable[int]=ACCUMULATION_PERIODS,
                              start_at_zero=False, var_label: Optional[str]=None,
                              glue_label: Optional[str]=None) -> None:
    """ Plot accumulated time series for variable `var` in multiple accumulation periods, in one `site`. """
    # Select data in site
    data_site = data.sel(**site)

    # Create figure
    fig, ax = plt.subplots(figsize=(12, 6), constrained_layout=True)

    # Plot data for each accumulation period
    # Consistent colours, from Paul Tol's scheme [https://sronpersonalpages.nl/~pault/]
    line_colours = ["#332288", "#44AA99", "#117733", "#999933", "#DDCC77", "#CC6677", "#882255", "#AA4499"]
    for period, colour in zip(accumulation_periods, line_colours):
        period_var = f"{var}{period}"
        data_site[period_var].plot(ax=ax, label=f"{period:2d} months", c=colour)

    # Decorate figure
    ax.grid(True)
    ax.set_title(f"{var_label} at ({site['lat']} °N, {site['lon']} °E) accumulated over different periods")
    ax.set_xlabel("Time")
    ax.autoscale(enable=True, axis="x", tight=True)
    ax.set_ylabel(f"Accumulated {var_label}")
    ax.legend(title="Accumulation\nperiod", reverse=True, loc="best")
    if start_at_zero:  # Start y-axis at 0, e.g. for total precipitation
        ax.set_ylim(ymin=0)
    else:              # If values can be + or -, show the 0-line clearly
        plot_zero_line(ax)      

    # Show result
    _glue_or_show(fig, glue_label)


# Plot tp, wb with preset names
plot_accumulated_precipitation = partial(plot_accumulated_variable, var="tp", start_at_zero=True,  var_label="Total precipitation [mm]")
plot_accumulated_waterbalance  = partial(plot_accumulated_variable, var="wb", start_at_zero=False, var_label="Water balance [mm]")

The following functions produce time series comparisons between datasets, such as reproduced vs. ERA5–Drought SPI:

In [24]:
# Helper function: Display SPI / SPEI categories
def plot_index_categories(ax: plt.Axes, categories: Iterable[Iterable]) -> None:
    """ Display SPI / SPEI categories (e.g. "extreme drought") on an Axes panel. """
    for low, high, label, colour in categories:
        ax.axhspan(low, high, facecolor=colour, edgecolor=None, alpha=0.25)


# Main function: Plot time series of absolute values (left) and differences (right)
def plot_time_series_comparison(data1: xr.Dataset, data2: xr.Dataset, var: str, *,
                                accumulation_periods: Iterable[int]=ACCUMULATION_PERIODS,
                                var_categories: Optional[Iterable[Iterable]]=None,  # e.g. CATEGORIES_SPI
                                label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="",
                                glue_label: Optional[str]=None) -> None:
    """
    Plot time series of one variable (e.g. SPI) in two datasets.
    Left column: Overlapping time series.
    Right column: Differences (data2 – data1).

    One row for each accumulation period.
    `var` and `accumulation_periods` are provided manually, rather than inferred,
        to allow plotting of individual time series.
    """
    # Calculate difference
    difference = data2 - data1
    difference_label = f"{label2} – {label1}"

    # Setup: Figure
    ncols = 2
    nrows = len(accumulation_periods)  # Note: not checking if accumulation periods are actually present in data1, data2
    fig, axs = plt.subplots(nrows=nrows, ncols=ncols, sharex=True, sharey="col", squeeze=False,
                            layout="constrained", gridspec_kw={"wspace": 0.07}, figsize=(10, 2.7*nrows))

    # Setup: Styles for line plots
    timeseries_kwargs = [{"color": "tab:blue", "linestyle": "-", "label": label1},
                         {"color": "tab:orange", "linestyle": "dotted", "label": label2},
                        ]

    # Plot data
    for ax_row, period in zip(axs, accumulation_periods):
        var_period = f"{var}{period}"

        # Plot absolute time series
        for data, style in zip([data1, data2], timeseries_kwargs):
            data[var_period].plot(ax=ax_row[0], **style, zorder=2)

        # Display categories and 0 line
        plot_index_categories(ax_row[0], var_categories)
        plot_zero_line(*ax_row)

        # Plot difference
        difference[var_period].plot(ax=ax_row[1], color="#004488", zorder=2)
        md  = nanmedian(ravel(              difference[var_period]),  axis=0).compute()
        mad = nanmedian(ravel(xr.ufuncs.abs(difference[var_period])), axis=0).compute()
        _add_textbox_to_subplots(f"Median Δ: {md:+.4f}\nMedian |Δ|: {mad:.4f}", ax_row[1], right=True)

    # Decorate figure
    for ax in axs.ravel():
        ax.set_title(None)
        ax.grid(True)
        
    axs[0, 0].set_title(f"{var} values")
    axs[0, 1].set_title(f"Difference ({difference_label})")

    axs[0, 0].set_ylim(-8, 8)
    axs[0, 0].set_xlim(data1["time"].min().values, data1["time"].max().values)
    axs[0, 1].set_ylim(-1, 1)

    for ax in axs[:, 0]:
        ax.legend(loc="upper right")

    for ax in axs[:-1].ravel():
        ax.set_xlabel(None)
    for ax in axs[-1]:
        ax.set_xlabel("Time")
    for ax_row, period in zip(axs, accumulation_periods):
        ax_row[0].set_ylabel(f"{var}-{period}")
        ax_row[1].set_ylabel(f"{var}-{period} difference")

    fig.suptitle(f"{label1} vs. {label2}\nTime series for {var}{title_suffix}")
    fig.align_ylabels()

    # Show result
    _glue_or_show(fig, glue_label)


# Plot SPI, SPEI with preset names
plot_time_series_comparison_spi  = partial(plot_time_series_comparison, var="SPI",  var_categories=CATEGORIES_SPI)
plot_time_series_comparison_spei = partial(plot_time_series_comparison, var="SPEI", var_categories=CATEGORIES_SPEI)

The following functions produce confusion matrices for the SPI / SPEI categories, e.g. how many "extremely dry" points in the reproduced dataset are also classified as "extremely dry" in ERA5–Drought:

In [25]:
# Main function: Plot confusion matrices with counts (text) and fractions (colour)
def plot_confusion_matrices(data1: xr.Dataset, data2: xr.Dataset, var: str, var_categories: Iterable[Iterable], *,  # e.g. CATEGORIES_SPI
                            label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="",
                            glue_label: Optional[str]=None) -> None:
    """
    Plot confusion matrices of categories for one variable (e.g. SPI "extremely dry") in two datasets.
    One panel for each data_variable that occurs in both datasets and matches the variable `var`,
        e.g. different accumulation periods.
    """
    # Align datasets
    data1, data2 = align_data_variables(data1, data2, var=var)  # Ensure only matching variables
    data1, data2 = xr.align(data1, data2)  # Ensure only matching points
    # data1 = data1.transpose(*[dim for dim in data2.dims])  # Ensure same order of dimensions
    data1, data2 = [data.stack(point=data2.dims) for data in (data1, data2)]  # Make 1D list

    # Apply categorisation
    categories1, categories2 = [categorise_dataset(data, var_categories) for data in (data1, data2)]

    # Create figure
    n_categories = len(var_categories)
    category_index = np.arange(n_categories)
    n_datavars = len(data2.data_vars)
    ncols = 2
    nrows = (n_datavars // ncols) + 1
    fig, axs = plt.subplots(nrows=nrows, ncols=ncols, figsize=(5*ncols, 4*nrows),
                            gridspec_kw={"hspace": 0.01, "wspace": 0.01}, layout="constrained")

    # Loop over data variables
    for ax, data_var in zip(axs.ravel(), data2.data_vars):
        # Create confusion matrix from categorisation values
        matrix_absolute = confusion_matrix(categories1[data_var], categories2[data_var], labels=category_index+1)
        matrix_relative = confusion_matrix(categories1[data_var], categories2[data_var], labels=category_index+1, normalize="true")  # Normalised by rows (data1)
        # For operational code, you would add an assert here to check that the sum of elements in matrix_absolute
        # corresponds to the number of not-NaN elements of the input data

        # Plot fractions for color background
        image = ax.imshow(matrix_relative, cmap=plt.cm.Blues.resampled(10), vmin=0.0, vmax=1.0)

        # Annotate with absolute counts
        for i in category_index:
            for j in category_index:
                counts_abs, counts_rel = matrix_absolute[i, j], matrix_relative[i, j]
                ax.text(j, i, f"{counts_abs:.0f}", ha="center", va="center",  # Add text
                        color="white" if counts_rel > 0.5 else "black",       # Colour based on background
                        fontsize=9, clip_on=True)                             # Text settings

        # Label based on data variable, adding a hyphen
        data_var_hyphenated = data_var.replace(var, var+"-")
        ax.set_title(data_var_hyphenated)

    # Add category labels
    category_labels = [category[2] for category in var_categories]
    for ax in axs.ravel():
        ax.set_xticks(category_index, labels=category_labels, rotation=30, ha="right", fontsize=9)
        ax.set_yticks(category_index, labels=category_labels, fontsize=9)
        ax.grid(False)
        ax.xaxis.set_inverted(True)

    # Add a single shared colorbar showing row-wise fraction
    cbar = fig.colorbar(image, ax=axs, location="right", fraction=0.05, pad=0.05)# shrink=0.6)
    cbar.set_label(f"Fraction of {label1} data (rows)")

    # Hide extra panels if odd number of variables
    for ax in axs.ravel()[n_datavars:]:
        ax.set_visible(False)

    # Decorate figure
    fig.suptitle(f"{label1} vs. {label2}\nConfusion matrices for {var}{title_suffix}")
    fig.supxlabel(label2, fontweight="bold", fontsize=16)
    fig.supylabel(label1, fontweight="bold", fontsize=16)

    # Show result
    _glue_or_show(fig, glue_label)


# Plot SPI, SPEI with preset names
plot_confusion_matrices_spi  = partial(plot_confusion_matrices, var="SPI",  var_categories=CATEGORIES_SPI)
plot_confusion_matrices_spei = partial(plot_confusion_matrices, var="SPEI", var_categories=CATEGORIES_SPEI)

The following functions display geospatial comparisons between index values:

In [26]:
# Main function: Plot maps of absolute values (left, middle) and differences (right)
def plot_geospatial_comparison(data1: xr.Dataset, data2: xr.Dataset, var: str, time: str, *,
                               label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="",
                               domain: AnyDomain=DOMAIN_GLOBAL,
                               time_dimension: str="time",
                               glue_label: Optional[str]=None) -> None:
    """
    Plot geospatial views of categories for one variable (e.g. SPI "extremely dry") in two datasets.
    One panel for each data_variable that occurs in both datasets and matches the variable `var`,
        e.g. different accumulation periods.
    """
    # Select data for one timestamp
    data1, data2 = [data.sel({time_dimension: time})
                    for data in (data1, data2)]

    # Only look at variables that are in both datasets
    # Note: Not checking for matching coordinates / xr.align
    data1, data2 = align_data_variables(data1, data2, var=var)

    # Calculate difference
    difference = data2 - data1
    difference_label = f"{label2} – {label1}"

    # Setup: Figure
    nrows = len(data2.data_vars)
    ncols = 3  # data1, data2, diff
    fig = ekp.Figure(rows=nrows, columns=ncols, figsize=(4*ncols, 3.7*nrows))

    # Loop over variables (e.g. accumulation periods)
    for data_var in data2.data_vars:
        # Plot index
        for data in (data1, data2):
            subplot = fig.add_map(domain=domain)
            subplot.grid_cells(data, z=data_var, style=styles[var])

        # Plot difference
        subplot_diff = fig.add_map(domain=domain)
        subplot_diff.grid_cells(difference, z=data_var, style=styles[var+"_diff"])

    # Label dataset at the top
    for subplot, label in zip(fig.subplots[:ncols], [label1, label2, difference_label]):
        subplot.title(label)

    # Label indicator in the corner
    for subplots, data_var in zip(batched(fig.subplots, ncols), data2.data_vars):
        data_var_hyphenated = INDEXES_NAMED[data_var]
        _add_textbox_to_subplots(data_var_hyphenated, *subplots)

    # Legend at the bottom
    for subplot in fig.subplots[-ncols:]:
        subplot.legend(label=var)

    # Decorate figure
    time_for_title = time[:7] # Could be changed to proper datetime format, e.g. %B %Y
    title = f"{label1} vs. {label2}\nGeospatial comparison for {var} ({domain.name}, {time_for_title}){title_suffix}"
    decorate_fig(fig, title=title)

    # Show result
    _glue_or_show(fig.fig, glue_label)

The following functions display geospatial comparisons between quality flags:

In [27]:
# Main function: Plot maps of absolute values (left, middle) and differences (right)
def plot_geospatial_comparison_quality_flags(var: str, *,
                                             probabilities: Optional[dict[str, Iterable[xr.Dataset]]]={},  # e.g. p0
                                             masks:         Optional[dict[str, Iterable[xr.Dataset]]]={},  # e.g. p0 < 0.33 or alpha > 0.05
                                             label1: str="ERA5–Drought", label2: str="Reproduced", title_suffix: Optional[str]="",
                                             example_month: Optional[int]=None,  # e.g. 12 for December
                                             flag_label: Optional[str]=None,
                                             domain: AnyDomain=DOMAIN_GLOBAL, shared_mask: Optional[xr.DataArray]=True,
                                             month_dimension: str="month",
                                             glue_label: Optional[str]=None) -> None:
    """
    Plot geospatial views of pre-calculated quality flags in two datasets.
    probabilities are datasets with quality flag probabilities.
        These are ingested as a dict with str keys (the label for that mask) and an Iterable of xr.Datasets.
        These are displayed for variable `var` (e.g. tp3, SPEI3) in `example_month` (e.g. 12).
    masks created from the quality flags can be included, e.g. where p0 <= 0.33.
        These are ingested as a dict with str keys (the label for that mask) and an Iterable of xr.Datasets.
        Following Keune+25 Fig 3, masks are displayed as their sum over all 12 months (left, middle)
        as well as the number of mismatched months (right).
    An additional `shared_mask`, e.g. a land-sea mask, can be applied to all panels.
    """
    # Setup: Labels
    difference_label = f"{label2} – {label1}"

    # Setup: Types of data to plot
    n_probabilities, n_masks = len(probabilities), len(masks)
    assert n_probabilities or n_masks, "No data provided to plot_geospatial_comparison_quality_flags."

    # Setup: Figure
    nrows = n_probabilities + n_masks  # 1 each per probability (generally 0 or 1) + 1 each per mask
    ncols = 3  # data1, data2, diff
    figsize = (4*ncols, 1.5+3*nrows) if domain.name == "Global" else (4*ncols, 1.5+3.7*nrows)  # Adjust aspect ratio for global plots
    fig = ekp.Figure(rows=nrows, columns=ncols, figsize=figsize)

    # Plot probabilities (if any)
    for key, list_of_datasets in probabilities.items():
        # Select data for one month
        assert example_month in MONTHS, f"Cannot use example month `{example_month}`; please use a number from 1 through 12."
        month_label = MONTHS_NAMED[example_month]
        list_of_datasets = [prob.sel({month_dimension: example_month}) for prob in list_of_datasets]

        # Calculate difference
        probability_difference = xr.ufuncs.subtract(*list_of_datasets[::-1])  # data2 - data1

        # Create and fill panels
        subplots = [fig.add_map(domain=domain) for j in range(ncols)]

        for subplot, prob in zip(subplots, list_of_datasets):
            subplot.grid_cells(prob.where(shared_mask), z=var, style=styles["probability"])
        subplots[-1].grid_cells(probability_difference.where(shared_mask), z=var, style=styles["probability_diff"])

        # Add colour bars
        subplots[0].legend(label=f"{key}\n{month_label}", location="left")
        subplots[-1].legend(label="Difference", location="right")

    # Plot masks (if any)
    for key, list_of_datasets in masks.items():
        # Create and fill panels
        subplots = [fig.add_map(domain=domain) for j in range(ncols)]

        for subplot, mask in zip(subplots, list_of_datasets):
            # Add up per month and invert (to get number of *flagged* rather than *allowed* points)
            flagged_months = count_flagged_months(mask)

            # Plot
            subplot.grid_cells(flagged_months.where(shared_mask), z=var, style=styles["flag_summed"])

        # Find and plot mismatched months
        mask1, mask2 = list_of_datasets
        masks_not_matching = (mask1 != mask2)
        months_not_matching = count_flagged_months(masks_not_matching, invert=False)
        subplots[-1].grid_cells(months_not_matching.where(shared_mask), z=var, style=styles["flag_summed"])

        # Add colour bars
        subplots[0].legend(label="Flagged months", location="left")
        subplots[-1].legend(label="Mismatched months", location="right")

        # Label masks in the corner
        _add_textbox_to_subplots(key, *subplots)

    # Label dataset at the top
    for subplot, label in zip(fig.subplots[:ncols], [label1, label2, difference_label]):
        subplot.title(label)

    # Decorate figure
    var = INDEXES_NAMED[var] if var in INDEXES_NAMED else var  # e.g. SPI1 to SPI-1, if possible
    title = f"{label1} vs. {label2}\nGeospatial comparison of {flag_label}\n({domain.name}, {var}){title_suffix}"
    decorate_fig(fig, title=title)

    # Show result
    _glue_or_show(fig.fig, glue_label)

(indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup)=
### 2. General setup
This section provides some of the setup for the further analysis,
including
the timespan and sites to investigate
as well as
the CDS data downloads.
This ensures that the following sections
(SPI, SPEI, etc.)
can be run independently.

#### 2.1 Analysis setup
In this assessment,
we will calculate SPI and SPEI for the years 1940–2024.
For the reference period,
we will use the World Meteorological Organization (WMO) current standard 30-year reference period of 1991–2020,
which is also used in ERA5–Drought.
Both of these date ranges can be adjusted in the cell below when running the analysis yourself:

In [28]:
# Define your preferred analysis and reference periods
years           = (1940, 2024)  # Years for the analysis (inclusive)
years_reference = (1991, 2020)  # Years for the reference period (inclusive)
year_snapshot   = 2024          # Year for example region geospatial analysis

# Derived variables for convenience:
reference_window = {"time": slice(f"{years_reference[0]}-01-01", f"{years_reference[1]}-12-01"),}  #  Slice (1991-01-01, 2020-12-01)
entire_window    = {"time": slice(f"{years[0]}-01-01",           f"{years[1]}-12-01"),}            #  Slice (1940-01-01, 2024-12-01)

Some parts of the analysis will be performed globally, others in specific sites for computational reasons.
This notebook uses Addis Ababa in Ethiopia (9.00 °N, 38.75 °E) and the Horn of Africa region around it as an example;
a different site can be chosen when running the notebook yourself by editing the cell below:

In [29]:
# Define your preferred site for the time series analysis
example_site = {"lat": 9.00, "lon": 38.75}  # Compatible with ERA5–Drought and pre-processed ERA5 data

# Define the size and name of the surrounding region
example_region_size = 12  # Degrees to either side of the example side
label_region = "Horn of Africa"

# Derived variables for convenience
# Example site
label_site = f"({example_site['lat']:.2f} °N, {example_site['lon']:.2f} °E)"
request_site = request_data_for_one_site(**example_site)

# Example region
example_region = {"lat": slice(example_site["lat"] + example_region_size, example_site["lat"] - example_region_size),  # Decreasing order
                  "lon": slice(example_site["lon"] - example_region_size, example_site["lon"] + example_region_size),} # Increasing order
request_region = request_data_for_one_site(**example_site, half_width=example_region_size)
domain_region = Domain(
    bbox=[example_region["lon"].start, example_region["lon"].stop, example_region["lat"].start, example_region["lat"].stop],
    name=label_region,
)

#### 2.2 CDS download setup
Having defined our target years, we can now define our CDS request.
First, we define templates with some default parameters
(e.g. years, data format)
that will also be used later in the notebook.
Additional information for specific downloads
(e.g. variable, data stream)
is mixed into this template where relevant.

This notebook uses [earthkit-data](https://github.com/ecmwf/earthkit-data) to download files from the CDS.
If you intend to run this notebook multiple times, it is highly recommended that you [enable caching](https://earthkit-data.readthedocs.io/en/latest/concepts/caching.html) to prevent having to download the same files multiple times.
If you prefer not to use earthkit, the following requests can also be used with the [cdsapi module](https://cds.climate.copernicus.eu/how-to-api#linux-use-client-step).
In either case (earthkit-data or cdsapi), it is required to set up a CDS account and API key as explained [on the CDS website](https://cds.climate.copernicus.eu/how-to-api).

##### ERA5
We start by setting up a template for requests from the [_Complete ERA5 global atmospheric reanalysis_](https://doi.org/10.24381/cds.143582cf) dataset, from which we will obtain precipitation and (for SPEI) potential evapotranspiration:

In [30]:
ID_ERA5 = "reanalysis-era5-complete"

request_era5_template = {
    "class": "ea",            # Default for ERA5
    # Dates: ERA5 takes these in the format 19400101/19400201/.../20241101/20241201
    # The following lines generate a string in said format for the chosen year range
    "date": "/".join(f"{year}{month:02}01"                    # yyyymm01 format
                     for year in range(years[0], years[1]+1)  # All years in specified range, inclusive
                     for month in MONTHS),                    # All calendar months
    "expver": "1",            # ERA5 consolidated data
    "levtype": "sfc",         # Surface
    "grid": "0.25/0.25",      # Grid: 0.25° by 0.25° (interpolated from native)
    "type": "fc",             # Forecast
    "data_format": "netcdf",  # NetCDF data
}

##### ERA5–Drought
We also set up a template for requests from ERA5–Drought ([_Monthly drought indices from 1940 to present derived from ERA5 reanalysis_](https://doi.org/10.24381/9bea5e16)):

In [31]:
ID_ERA5_DROUGHT = "derived-drought-historical-monthly"

# General request template
request_era5drought_template = {
    "version": "1_0",                                # Current version
    "dataset_type": "consolidated_dataset",          # Only use consolidated data, i.e. not ERA5T-derived
    "product_type": ["reanalysis"],                  # Reanalysis by default, can be overridden in ensemble section
    "month": [f"{month:02d}" for month in MONTHS],   # All calendar months
}

# Request for SPI or SPEI data
request_era5drought_index = {
    "accumulation_period": [str(p) for p in ACCUMULATION_PERIODS],
    "year": [f"{year}" for year in range(years[0], years[1]+1)],    
} | request_era5drought_template

# Request for quality flags
request_era5drought_flag = request_era5drought_template

# Request for SPI/SPEI ensemble data
request_era5drought_index_ensemble = request_era5drought_index | {"product_type": ["ensemble_members"],}

#### 2.3 Download land-sea mask
ERA5–Drought uses a land-sea mask to only provide values over land.
Here, we download the [ERA5 land-sea mask](https://confluence.ecmwf.int/x/LJAlK) from the [_ERA5 hourly data on single levels from 1940 to present_](https://doi.org/10.24381/cds.adbb2d47) dataset:

In [32]:
ID_ERA5_LANDSEAMASK = "reanalysis-era5-single-levels"

request_landsea_mask = {
    "product_type": "reanalysis",
    "variable": "land_sea_mask",
    "date": "2000-01-01",  # Does nothing but is required in CDS form
    "time": "00:00",       # Does nothing but is required in CDS form
    "format": "netcdf",
    "download_format": "zip",
}

# Download mask
LAND = ekd.from_source("cds", ID_ERA5_LANDSEAMASK, request_landsea_mask)
LAND = LAND.to_xarray()  # Convert to xarray dataset

# Convert longitude from 0..360 to –180..180
LAND = rename_era5_dimensions(LAND)
LAND = longitude_360_to_180(LAND, "lon")

# Drop time dimension
LAND = LAND.squeeze("time")

# Convert to boolean mask: Land if > 0.5 (following ERA5 convention)
LAND = (LAND["lsm"] > 0.5) # Land considered to be full

(indicator_derived-drought-historical-monthly_consistency_q01:section-spi)=
### 3. SPI comparison

#### 3.1 Download monthly precipitation data from ERA5
First, the monthly-mean total precipitation data from the ERA5 reanalysis are downloaded.
Generally, one would use the [_ERA5 monthly averaged data on single levels from 1940 to present_](https://doi.org/10.24381/cds.f17050d7) dataset for this, which provides pre-calculated monthly means at 0.25° by 0.25° resolution.
For this assessment,
to be as close to the ERA5–Drought data processing pipeline as possible
and
to make use of some of MARS's functionalities (see [](indicator_derived-drought-historical-monthly_consistency_q01:section-ensemble)),
we instead use the [_Complete ERA5 global atmospheric reanalysis_](https://doi.org/10.24381/cds.143582cf) dataset.

We want to download 
total precipitation data (variable `228.128`)
from the
`moda` stream (monthly-mean reanalysis data),
so we mix this information into the request template set up [previously](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup)
and submit the request to the CDS.
More information about the format for these requests is available in the [MARS ERA5 catalogue](https://apps.ecmwf.int/data-catalogues/era5/?class=ea).

In [33]:
request_era5_precipitation_moda = {
    "param": "228.128",  # Variable: Total precipitation
    "stream": "moda",    # Data stream: Monthly mean reanalysis
} | request_era5_template

In [34]:
# Download data and load into xarray
data_era5_precipitation_cds = ekd.from_source("cds", ID_ERA5, request_era5_precipitation_moda)  # Download as field list
data_era5_precipitation_cds = data_era5_precipitation_cds.to_xarray(chunks={"valid_time": -1})  # Convert to xarray dataset, with Dask

# Pre-process to desired format
# Note the change in variable name
data_era5_precipitation_preprocessed = preprocess_era5(data_era5_precipitation_cds)

# Display in notebook
data_era5_precipitation_preprocessed

<xarray.Dataset> Size: 4GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B ...
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
Data variables:
    tp       (time, lat, lon) float32 4GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
Attributes:
    GRIB_centre:             ecmf
    GRIB_centreDescription:  European Centre for Medium-Range Weather Forecasts
    GRIB_subCentre:          0
    Conventions:             CF-1.7
    institution:             European Centre for Medium-Range Weather Forecasts

#### 3.2 Calculate total precipitation over accumulation periods
As explained above,
SPI and SPEI are commonly evaluated over different accumulation periods.
ERA5–Drought provides both indices for periods of 1, 3, 6, 12, 24, 36, and 48 months.
Here, we perform this accumulation by calculating the total precipitation over the previous _p_ months
at every coordinate and timestamp in the ERA5 data,
for each accumulation period _p_.
The implementation used here
(which can be found in [](indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup))
accounts for the variable number of days in each month,
including leap years.

The resulting accumulated time series for the site defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup),
Addis Ababa in Ethiopia in our example,
are displayed in Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-tp-accumulated>`.
This example clearly shows how shorter accumulation periods probe short-term effects such as seasonality,
which are smoothed out in longer periods.

In [35]:
# Accumulate total precipitation
data_era5_precipitation = accumulate(data_era5_precipitation_preprocessed, "tp")

# Display result
data_era5_precipitation

<xarray.Dataset> Size: 59GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B ...
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
Data variables:
    tp1      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp3      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp6      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp12     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp24     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp36     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp48     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
Attributes:
    GRIB_centre:             ecmf
    GRIB_centreDescription:  European Centre for Medium-Range Weather Forecasts
    GRIB_subCentre:          0
    Conventions:             CF-1.7
    institution:             European Centre for Medium-Range Weather Forecasts

In [36]:
# Display accumulated precipitation at example site
plot_accumulated_precipitation(data_era5_precipitation, example_site,
                               glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-tp-accumulated")

```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-tp-accumulated
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-tp-accumulated"

Total precipitation from ERA5 accumulated over different periods, for the example site of Addis Ababa, Ethiopia.
```

#### 3.3 Fit gamma distribution by calendar month
At the core of SPI is the assumption that (monthly) total precipitation values follow a gamma distribution.
Here, this distribution is fitted to data within the reference period (1991–2020 by default, see above).
A separate distribution is fitted for each calendar month,
i.e.
we fit one distribution for all 30 Januaries in the reference period,
another for all 30 Februaries,
and so on.
This separation allows the resulting index to account for seasonal differences.
This fitting process is then repeated for each accumulation period.

Here, we use
[scipy.stats.gamma](https://docs.scipy.org/doc/scipy/reference/generated/scipy.stats.gamma.html)
to fit the gamma distribution.
This returns three parameters for each calendar month and accumulation period, namely
shape (_α_), location (_μ_), and scale (_β_).

In [37]:
# Select data in reference window
data_era5_precipitation_reference = data_era5_precipitation.sel(**reference_window)

# Fit gamma distribution
spi_parameters = fit_monthly_spi(data_era5_precipitation_reference)

# Display result
spi_parameters

<xarray.Dataset> Size: 2GB
Dimensions:  (month: 12, lat: 721, lon: 1440, stat: 3)
Coordinates:
    number   int64 8B ...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Dimensions without coordinates: stat
Data variables:
    tp1      (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp3      (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp6      (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp12     (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp24     (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp36     (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>
    tp48     (month, lat, lon, stat) float64 299MB dask.array<chunksize=(12, 103, 360, 3), meta=np.ndarray>

The observed (accumulated) total precipitation values along the entire time series
(1940–2024 in our example)
are then compared to the fitted parameters.
This is quantified in terms of where the observed values fall on the cumulative distribution function (CDF):

$$
P(X \leq x) = F_X(x ; \alpha, \mu, \beta) = \int_{-\infty}^{x}f(y ; \alpha, \mu, \beta) \, \text{d}y
$$

Where
_P(X ≤ x)_ is the probability for a randomly drawn total precipitation _X_ to be equal to or less than the observed value _x_;
_F{sub}`X`_ is the CDF for a gamma distribution with shape _α_, location _µ_, and scale _β_;
and
the CDF is equal to the integral of the corresponding probability density function up to _x_.

As before, there is a distribution for each calendar month, for each accumulation period.

Note that actually evaluating the CDF
– as opposed to [queueing it up in dask](https://docs.xarray.dev/en/stable/user-guide/dask.html), as done here –
can be slow, especially for a large dataset like global ERA5 precipitation.
As such, if you are interested in a subset of the data,
such as a specific site or period in time,
it may be best to subset your data _before_ calculating the CDF rather than afterwards.
An example of this is provided below in the comparison with ERA5–Drought SPI.

In [38]:
# Compute CDF time series
cdf = compute_cdf_spi(data_era5_precipitation, spi_parameters)

# Display result
cdf

<xarray.Dataset> Size: 59GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
    month    (time) int64 8kB dask.array<chunksize=(1020,), meta=np.ndarray>
Data variables:
    tp1      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp3      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp6      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp12     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp24     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp36     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    tp48     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
Attributes:
    GRIB_centre:             ecmf
    GRIB_centreDescription:  European Centre for Medium-Range Weather Forecasts
    GRIB_subCentre:          0
    Conventions:             CF-1.7
    institution:             European Centre for Medium-Range Weather Forecasts

#### 3.4 Adjust for months with zero precipitation
Sometimes, zero (or near-zero) monthly precipitation is observed,
particularly in dry areas like deserts.
Maintaining the desired statistics,
such as the mean SPI in the reference period being 0,
requires adjusting the CDF to account for these zero-precipitation months.

ERA5–Drought follows the [[Stagge+15](https://doi.org/10.1002/joc.4267)] method to adjust the CDF.
First, the probability of zero precipitation is calculated as follows:

$$
\bar{p_0} = \frac{n_0 + 1}{2 (n + 1)}
$$

where
_n{sub}`0`_ is the number of months with zero precipitation in the reference period,
and
_n_ is the total number of months in the reference period (here 30 for 1991–2020).
While some datasets define "zero precipitation" using a slightly higher threshold
(e.g. less than 0.1 mm)
to account for measurement uncertainty,
ERA5–Drought uses a threshold of exactly 0 mm total precipitation in the underpinning ERA5 data.

Having calculated the probability of zero precipitation, the CDF is adjusted as follows:

$$
F'_X(x ; \alpha, \mu, \beta) =
\begin{cases}
\bar{p_0} + (1 - \bar{p_0}) \, F_X(x; \alpha, \mu, \beta), & x > 0, \\
\frac{n_0 + 1}{2(n+1)}, & x = 0
\end{cases}
$$

As before, this adjustment is carried out individually for each calendar month and accumulation period.

In [39]:
# Adjust CDF
cdf_adjusted = adjust_cdf_for_zero_precipitation(cdf, data_era5_precipitation_reference)

# Display result
cdf_adjusted

<xarray.Dataset> Size: 59GB
Dimensions:  (lat: 721, lon: 1440, time: 1020)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
    month    (time) int64 8kB dask.array<chunksize=(1020,), meta=np.ndarray>
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
Data variables:
    tp1      (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp3      (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp6      (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp12     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp24     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp36     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    tp48     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>

#### 3.5 Compute SPI
Finally,
SPI values
for each data point (latitude, longitude, time)
are calculated from the adjusted CDF values _F'{sub}`X`_ by transforming to a standard normal distribution.
The function [scipy.stats.norm.ppf](https://docs.scipy.org/doc/scipy/reference/generated/scipy.stats.norm.html) is used to calculate the inverse CDF _Φ{sup}`-1`_ of the normal distribution:

$$
\text{SPI}(x) = \Phi^{-1}\left(F'_X(x ; \alpha, \mu, \beta)\right)
$$

In [40]:
# Calculate SPI from adjusted CDF
spi_reproduced = cdf_to_spi(cdf_adjusted)

# Display result
spi_reproduced

<xarray.Dataset> Size: 59GB
Dimensions:  (lat: 721, lon: 1440, time: 1020)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
    month    (time) int64 8kB dask.array<chunksize=(1020,), meta=np.ndarray>
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
Data variables:
    SPI1     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI3     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI6     (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI12    (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI24    (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI36    (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>
    SPI48    (lat, lon, time) float64 8GB dask.array<chunksize=(103, 360, 1020), meta=np.ndarray>

#### 3.6 SPI comparison: Time series in example site
Having reproduced the SPI index from ERA5 precipitation data following the ERA5–Drought methodology,
we can now compare the results to determine the reproducibility of ERA5–Drought.
We first compare the datasets over time at the example site defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).

The previous sections set up the SPI reproduction pipeline for the entire ERA5 precipitation dataset (global, 1940–2024).
Because actually executing said calculation takes a long time,
as noted in the CDF subsection,
here we sub-select the downloaded ERA5 precipitation data and calculate SPI for the example site only.
For convenience, the full SPI pipeline is wrapped into a single `calculate_spi_from_era5` function,
as defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup).

Note that while the two may seem equivalent,
downloading the ERA5 precipitation data for the example site only and then running the SPI pipeline,
rather than downloading the entire dataset and subselecting for the example site,
produces different results.
This is likely caused by the inner workings of the MARS regridding function.
For consistency with ERA5–Drought, it is necessary to download the global ERA5 dataset and subselect.

In [41]:
# Select only desired site
data_era5_precipitation_site = data_era5_precipitation_preprocessed.sel(**example_site)
data_era5_precipitation_site.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Calculate SPI
spi_reproduced_site = calculate_spi_from_era5(data_era5_precipitation_site, reference_window=reference_window)

# Display result
spi_reproduced_site

<xarray.Dataset> Size: 73kB
Dimensions:  (time: 1020)
Coordinates:
    number   int64 8B 0
    lat      float64 8B 9.0
    lon      float64 8B 38.75
    month    (time) int64 8kB 1 2 3 4 5 6 7 8 9 10 11 ... 3 4 5 6 7 8 9 10 11 12
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
Data variables:
    SPI1     (time) float64 8kB 0.7613 2.721 1.463 0.6379 ... 2.096 1.176 -2.347
    SPI3     (time) float64 8kB nan nan 2.882 1.848 ... 1.84 1.924 2.213
    SPI6     (time) float64 8kB nan nan nan nan ... 0.006403 0.8926 1.579
    SPI12    (time) float64 8kB nan nan nan nan ... -0.7337 0.2018 0.2531 0.2907
    SPI24    (time) float64 8kB nan nan nan nan nan ... 1.287 1.908 1.99 2.049
    SPI36    (time) float64 8kB nan nan nan nan ... 0.6232 0.9572 1.038 1.063
    SPI48    (time) float64 8kB nan nan nan nan ... 0.3044 0.9269 0.9871 1.017

Next, we download the corresponding data from ERA5–Drought.
Because of size limits on the CDS,
the time series must be downloaded in parts:

In [42]:
# Main request, based on template and example site
request_era5drought_spi = {
    "variable": ["standardised_precipitation_index"],
} | request_era5drought_index | request_site

# Split into batches of up to 20 years each
subrequests_era5drought_spi = batch_requests(request_era5drought_spi, n=20)

# Download data and load into xarray
spi_era5drought_site = ekd.from_source("cds", ID_ERA5_DROUGHT, *subrequests_era5drought_spi)
spi_era5drought_site = spi_era5drought_site.to_xarray(join="outer")
spi_era5drought_site.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Select only desired site (remove margins)
spi_era5drought_site = spi_era5drought_site.sel(**example_site)

# Display result
spi_era5drought_site

  0%|          | 0/5 [00:00<?, ?it/s]

<xarray.Dataset> Size: 65kB
Dimensions:  (time: 1020)
Coordinates:
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
    lat      float64 8B 9.0
    lon      float64 8B 38.75
Data variables:
    SPI12    (time) float64 8kB nan nan nan nan ... -0.7337 0.2018 0.2531 0.2907
    SPI1     (time) float64 8kB 0.7613 2.721 1.463 0.6379 ... 2.096 1.176 -2.347
    SPI24    (time) float64 8kB nan nan nan nan nan ... 1.287 1.908 1.99 2.049
    SPI36    (time) float64 8kB nan nan nan nan ... 0.6271 0.9572 1.038 1.066
    SPI3     (time) float64 8kB nan nan 2.882 1.848 ... 1.838 1.924 2.213
    SPI48    (time) float64 8kB nan nan nan nan ... 0.3044 0.9269 0.9871 1.017
    SPI6     (time) float64 8kB nan nan nan nan ... 0.006403 0.8926 1.579
Attributes: (12/19)
    title:                   SPI12
    description:             Drought Index: Standardized Drought Index calcul...
    Conventions:             CF-1.8
    history:                 Created 13/08/2024 14:50:11 using DRYFALL.
    institution:             European Centre for Medium-Range Weather Forecasts
    source:                  DRYFALL v1.0
    ...                      ...
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    ref_publication:         Keune, J., Di Giuseppe, F., Barnard, C., Damasio...
    cds_data_catalogue_url:  https://cds.climate.copernicus.eu/datasets/deriv...
    product_type:            Reanalysis
    dataset_type:            Consolidated dataset

First, we examine the per-point difference in SPI between ERA5–Drought and the reproduction.
This comparison is performed separately for each calendar month and each accumulation period
to reflect the fitting process.
We calculate the median difference MΔ and median absolute difference M|Δ|,
as well as the percentage of match-ups where |Δ| ≥ 0.10:

In [43]:
# Calculate SPI median differences
spi_difference_site = comparison_monthly_statistics(spi_era5drought_site, spi_reproduced_site)

# Display with style
display_monthly_statistics(spi_difference_site)

It is clear from the table above that there is good agreement between the reproduced SPI values and those retrieved from ERA5–Drought.
The median difference and median absolute difference are 0 for the vast majority of month–accumulation period pairs,
and always ≤ 0.004.
Similarly,
the number of match-ups where the absolute difference is over our threshold of 0.10 is very small
(≤2.4%, corresponding to 1 or 2 match-ups for the 1940–2024 time span)
or none at all.
Differences between months and between accumulation periods are due to the fitting process being applied independently to each.
There are no apparent patterns across the different accumulation periods,
such as a particular month always being problematic,
although these may be expected in other sites.

Comparing the SPI time series
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries>`)
shows that large differences occur only in isolated spikes,
generally at extreme values of SPI (below –3 or above +3) where extreme deviations (e.g. from –5 to –8) are not meaningful [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
As such, these spikes do not cause a difference in SPI classifications
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion>`).
The cause of these spikes is not clear,
since the underpinning data are the same and the similarity along the rest of the time series suggests that the fitted distributions are also (near-)equal.

In some cases,
such as SPI-36 and SPI-48 in Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries>`,
small regular differences are observed.
These tend to be periodic per year,
indicating that they correspond to individual calendar months.
For example, the table above shows that SPI-48 is equal between the two datasets in all months except June and August.
These differences are the result of small differences in the obtained fit parameters,
which are likely caused by small differences in the fitting procedure and initial conditions.
Sensitivity to initial conditions and the fitting procedure is inherent to this type of regression-based indicator
and does not indicate a meaningful discrepancy in the reproducibility of ERA5–Drought.

In [44]:
# Plot time series comparison (absolute values and differences)
plot_time_series_comparison_spi(spi_era5drought_site, spi_reproduced_site, title_suffix=f" at {label_site}",
                                glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries")

In [45]:
# Plot confusion matrix comparison
# e.g. are all "extremely dry" data in ERA5–Drought also "extremely dry" in the reproduction?
plot_confusion_matrices_spi(spi_era5drought_site, spi_reproduced_site, title_suffix=f" at {label_site}",
                            glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion")

::::{tab-set}
:::{tab-item} Time series
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
```
:::
:::{tab-item} Confusion matrix
:sync: confusion
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion"

Confusion matrices for SPI categories from ERA5–Drought vs. reproduced from ERA5, for the example site of Addis Ababa, Ethiopia, in 1940–2024.
```
:::
::::

#### 3.7 SPI comparison: Regional snapshot
Next, we investigate spatial patterns in SPI and the difference therein across a wider region around the example site.
This region is defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).
In this example, we look at part of the Horn of Africa using a box of 12° in all directions around Addis Ababa, Ethiopia.
To reduce computing requirements, the comparison is performed for one year only,
here 2024, again defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).

As in the time series comparison,
we subselect the desired data from ERA5 and calculate the corresponding SPI
and
download SPI from ERA5–Drought for the desired region and time span:

In [46]:
# Select only desired region
data_era5_precipitation_region = data_era5_precipitation_preprocessed.sel(**example_region)
data_era5_precipitation_region.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Window in which to evaluate SPI
evaluation_window = {"time": slice(f"{year_snapshot}-01-01", f"{year_snapshot}-12-01")}  #  Slice (2024-01-01, 2024-12-01)

# Calculate SPI – this step may take a long time, up to several hours, depending on computing resources available
spi_reproduced_region = calculate_spi_from_era5(data_era5_precipitation_region, reference_window=reference_window,
                                                evaluation_window=evaluation_window)

# Display result
spi_reproduced_region

<xarray.Dataset> Size: 6MB
Dimensions:  (lat: 97, lon: 97, time: 12)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
    month    (time) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
  * time     (time) datetime64[ns] 96B 2024-01-01T06:00:00 ... 2024-12-01T06:...
Data variables:
    SPI1     (lat, lon, time) float64 903kB -0.1624 3.593 1.108 ... 3.17 0.4002
    SPI3     (lat, lon, time) float64 903kB -0.245 3.741 2.591 ... 0.06631 4.805
    SPI6     (lat, lon, time) float64 903kB -0.6493 2.887 2.65 ... 0.3048 8.21
    SPI12    (lat, lon, time) float64 903kB -0.04451 2.446 2.106 ... 1.48 1.157
    SPI24    (lat, lon, time) float64 903kB -0.8595 0.9775 ... 1.842 1.927
    SPI36    (lat, lon, time) float64 903kB 0.1276 1.128 1.252 ... 1.56 1.441
    SPI48    (lat, lon, time) float64 903kB 0.3765 1.085 1.104 ... 0.8568 1.085

In [47]:
# Main request, based on template and example region
request_era5drought_spi = {
    "variable": ["standardised_precipitation_index"],
} | request_era5drought_index | request_region

# Select only desired year
request_era5drought_spi = request_era5drought_spi | {"year": [f"{year_snapshot}"],}

# Download data and load into xarray
spi_era5drought_region = ekd.from_source("cds", ID_ERA5_DROUGHT, request_era5drought_spi)
spi_era5drought_region = spi_era5drought_region.to_xarray(compat="equals", join="outer")
spi_era5drought_region.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display result
spi_era5drought_region

<xarray.Dataset> Size: 6MB
Dimensions:  (time: 12, lat: 97, lon: 97)
Coordinates:
  * time     (time) datetime64[ns] 96B 2024-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
Data variables:
    SPI12    (time, lat, lon) float64 903kB -0.09726 -0.7002 -0.3001 ... nan nan
    SPI1     (time, lat, lon) float64 903kB -0.1624 -0.1624 -0.2035 ... nan nan
    SPI24    (time, lat, lon) float64 903kB -0.4692 -1.453 -0.9999 ... nan nan
    SPI36    (time, lat, lon) float64 903kB 0.1276 0.7199 -0.1568 ... nan nan
    SPI3     (time, lat, lon) float64 903kB -0.245 -0.245 -0.245 ... nan nan nan
    SPI48    (time, lat, lon) float64 903kB 0.3765 0.868 0.2973 ... nan nan nan
    SPI6     (time, lat, lon) float64 903kB -0.6493 0.04366 0.04044 ... nan nan
Attributes: (12/19)
    title:                   SPI12
    description:             Drought Index: Standardized Drought Index calcul...
    Conventions:             CF-1.8
    history:                 Created 30/10/2024 07:50:12 using DRYFALL.
    institution:             European Centre for Medium-Range Weather Forecasts
    source:                  DRYFALL v1.0
    ...                      ...
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    ref_publication:         Keune, J., Di Giuseppe, F., Barnard, C., Damasio...
    cds_data_catalogue_url:  https://cds.climate.copernicus.eu/datasets/deriv...
    product_type:            Reanalysis
    dataset_type:            Consolidated dataset

As before,
we examine the per-point difference in SPI between ERA5–Drought and the reproduction for each calendar month and each accumulation period:

In [48]:
# Calculate SPI median differences
spi_difference_region = comparison_monthly_statistics(spi_era5drought_region, spi_reproduced_region)

# Display with style
display_monthly_statistics(spi_difference_region)

As before, the differences between ERA5–Drought and reproduced SPI are small to zero in most cases.
Notably, differences of more than 0.10 appear in a larger number of match-ups than before,
more commonly for short accumulation periods than for long ones.
This is likely because the time series for longer accumulation periods are smoother,
which makes it easier for the fitting procedure to converge on the same optimal parameters.
There is no clear cause for certain months showing more difference than others,
such as local seasonal trends [[Gebrechorkos+19](https://doi.org/10.1038/s41598-019-47933-8)],
although the region may be too large and diverse to draw such correlations.

The distribution across the example region
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial>`)
shows that
for SPI-3 and longer, discrepancies are concentrated in deserts (Sahara, Arabian peninsula) where zero-precipitation months are common
and hence it is harder to appropriately fit SPI.
In fact,
many of these areas are flagged for low data quality or even not fitted at all in ERA5–Drought,
as discussed in the next subsection.
For SPI-1,
differences between the two datasets appear more randomly spread out.
Note that the grey area in the top left of the reproduced SPI-1 panel (Sudan) corresponds to NaN values,
i.e. areas where the fitting procedure could not converge at all.

The generally good agreement in SPI translates into good agreement in classification
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion-region>`),
although some pixels do get classified differently in ERA5–Drought vs. the reproduced dataset.
Mismatches occur mostly between adjacent categories
(e.g. "moderately wet" and "severely wet"),
although there are outliers in shorter accumulation periods;
some of these likely correspond to pixels where quality flags would normally be applied [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].

In [49]:
# Plot geospatial comparison: SPI in one region
plot_geospatial_comparison(spi_era5drought_region, spi_reproduced_region, var="SPI", time=f"{year_snapshot}-12-01",
                           domain=domain_region,
                           glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial")

In [50]:
# Plot confusion matrix comparison
# e.g. are all "extremely dry" data in ERA5–Drought also "extremely dry" in the reproduction?
plot_confusion_matrices_spi(spi_era5drought_region, spi_reproduced_region, title_suffix=f" in {label_region}",
                            glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion-region")

::::{tab-set}
:::{tab-item} Geospatial
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial"

SPI downloaded from ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference between the two (right), for the region around the example site of Addis Ababa, Ethiopia.
Only one month (December 2024) is displayed.
Colours correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
```
:::
:::{tab-item} Confusion matrix
:sync: confusion
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion-region
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-confusion-region"

Confusion matrices for SPI categories from ERA5–Drought vs. reproduced from ERA5, across the region around the example site of Addis Ababa, Ethiopia.
Combines data for all months within one year (2024).
```
:::
::::

#### 3.8 Quality flags: Probability of zero precipitation
One of the quality flags included in ERA5–Drought is the probability of zero precipitation _p{sub}`0`_.
This represents,
for each calendar month and accumulation period,
the fraction of months within the reference period (1991–2020) where precipitation was zero.
While the ERA5–Drought implementation of SPI accounts for months with zero precipitation by shifting the CDF,
as demonstrated above,
those months do skew the fitted distribution and reduce the reliability of the index.
In ERA5–Drought,
the gamma distribution is not even fitted if at least 10 out of 30 months in the reference window have 0 precipitation,
and the authors recommend that users filter out locations with a lower threshold, such as _p{sub}`0`_ > 0.1 [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].

Unlike the zero-precipitation correction,
this quality flag uses an unweighted probability, with _n{sub}`0`_ the number of months with zero precipitation and _n_ the total number of months in the reference window (30):

$$
p_0 = \frac{n_0}{n + 1}
$$

In this subsection, we reproduce the _p{sub}`0`_ quality flag and its derived masks,
and compare their values to those provided in ERA5–Drought.

In [51]:
# Accumulate total precipitation
data_era5_precipitation = accumulate(data_era5_precipitation_preprocessed, "tp")

# Select data in reference window
data_era5_precipitation_reference = data_era5_precipitation.sel(**reference_window)

# Calculate the probability of zero precipitation
p_zero_reproduced = probability_of_zero_precipitation(data_era5_precipitation_reference)
p_zero_reproduced.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display result
p_zero_reproduced

<xarray.Dataset> Size: 698MB
Dimensions:  (lat: 721, lon: 1440, month: 12)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    tp1      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp3      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp6      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp12     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp24     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp36     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp48     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0

The CDS provides ERA5–Drought's _p{sub}`0`_ flag for each accumulation period,
but does not distinguish between them in the variable name.
This means that _p{sub}`0`_ must be downloaded separately for each accumulation period, renamed, and merged together,
rather than downloading it for all simultaneously:

In [52]:
# Setup: Request for each accumulation period
request_p_zero = {
    "variable": ["probability_of_zero_precipitation_spi"],
} | request_era5drought_flag

requests_per_accumulation_period = {period: {"accumulation_period": [str(period)],}
                                    for period in ACCUMULATION_PERIODS}

subrequests_era5drought_p_zero = {period: (req | request_p_zero)
                                  for period, req in requests_per_accumulation_period.items()}

# Download data in individual requests
p_zero_era5drought = {period: ekd.from_source("cds", ID_ERA5_DROUGHT, subreq)  # Download as field lists
                      for period, subreq in subrequests_era5drought_p_zero.items()}

# Pre-process: Convert to xarray, handle variable names, month dimension
p_zero_era5drought = preprocess_era5drought_qualityflag(p_zero_era5drought, "tp")
p_zero_era5drought.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display in notebook
p_zero_era5drought

<xarray.Dataset> Size: 698MB
Dimensions:  (month: 12, lat: 721, lon: 1440)
Coordinates:
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    tp1      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp3      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp6      (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp12     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp24     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp36     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
    tp48     (month, lat, lon) float64 100MB 0.0 0.0 0.0 0.0 ... 0.0 0.0 0.0 0.0
Attributes: (12/21)
    CDI:                     Climate Data Interface version 1.9.10 (https://m...
    Conventions:             CF-1.8
    source:                  DRYFALL v1.0
    institution:             European Centre for Medium-Range Weather Forecasts
    title:                   Quality criteria for the derived standardized dr...
    description:             Monthly quality criteria that define the reliabi...
    ...                      ...
    climate_end_date:        2020-12-31
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    CDO:                     Climate Data Operators version 1.9.10 (https://m...
    product_type:            Consolidated Dataset
    dataset_type:            Reanalysis

For both datasets, we create masks corresponding to
the threshold for not fitting a gamma distribution (_p{sub}`0`_ > 0.33)
and
the recommended threshold for filtering data (_p{sub}`0`_ > 0.1):

In [53]:
# Create masks from p_zero
# True: below threshold, allowed
# False: above threshold, flagged
p_zero_reproduced_033  = (p_zero_reproduced  <= 0.33)
p_zero_era5drought_033 = (p_zero_era5drought <= 0.33)

p_zero_reproduced_010  = (p_zero_reproduced  <= 0.10)
p_zero_era5drought_010 = (p_zero_era5drought <= 0.10)

# Display result
p_zero_era5drought_033

<xarray.Dataset> Size: 87MB
Dimensions:  (lon: 1440, lat: 721, month: 12)
Coordinates:
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    tp1      (month, lat, lon) bool 12MB True True True True ... True True True
    tp3      (month, lat, lon) bool 12MB True True True True ... True True True
    tp6      (month, lat, lon) bool 12MB True True True True ... True True True
    tp12     (month, lat, lon) bool 12MB True True True True ... True True True
    tp24     (month, lat, lon) bool 12MB True True True True ... True True True
    tp36     (month, lat, lon) bool 12MB True True True True ... True True True
    tp48     (month, lat, lon) bool 12MB True True True True ... True True True
Attributes: (12/21)
    CDI:                     Climate Data Interface version 1.9.10 (https://m...
    Conventions:             CF-1.8
    source:                  DRYFALL v1.0
    institution:             European Centre for Medium-Range Weather Forecasts
    title:                   Quality criteria for the derived standardized dr...
    description:             Monthly quality criteria that define the reliabi...
    ...                      ...
    climate_end_date:        2020-12-31
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    CDO:                     Climate Data Operators version 1.9.10 (https://m...
    product_type:            Consolidated Dataset
    dataset_type:            Reanalysis

First,
we quantitatively compare how often the values of _p{sub}`0`_ and the derived masks in ERA5–Drought and the reproduction match:

In [54]:
# Package probability and masks into dictionary for table function; note use unicode symbols / HTML
p_zero_flags = {r"p<sub>0</sub> [%]":        [p_zero_era5drought,     p_zero_reproduced],
                r"p<sub>0</sub> > 0.33 [%]": [p_zero_era5drought_033, p_zero_reproduced_033],
                r"p<sub>0</sub> > 0.10 [%]": [p_zero_era5drought_010, p_zero_reproduced_010],
               }

# Compare probabilities per variable
compare_quality_flags(p_zero_flags, title_suffix=" (global)")

,tp1,tp3,tp6,tp12,tp24,tp36,tp48
Matching p0 [%],99.34,99.86,99.98,100.00,100.00,100.00,100.00
Matching p0 > 0.33 [%],99.87,99.98,100.00,100.00,100.00,100.00,100.00
Matching p0 > 0.10 [%],99.65,99.95,99.99,100.00,100.00,100.00,100.00


It is immediately evident from the table above that there is excellent agreement across all accumulation periods:
≥99% in all cases and 100% in most.
Since _p{sub}`0`_ is derived directly from the accumulated ERA5 total precipitation,
without any intermediate fitting steps,
the few discrepancies that do occur are likely caused by small differences in the data processing between ERA5–Drought and this notebook.
Potential examples include
the cut-off for zero precipitation (exactly 0 mm, 0.01 mm, or something else);
if the cut-off is not exactly zero, whether it is applied to the total or average precipitation in the accumulation period;
whether leap years are accounted for;
and computational factors like floating-point accuracy.
Given the level of agreement, it is safe to conclude that the _p{sub}`0`_ quality flag is reproducible.

The global distribution of _p{sub}`0`_ in the 3-month accumulation period
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-global>`)
shows that differences occur in isolated pixels,
e.g. in Argentina, Ukraine, and Russia,
rather than clusters.
Many pixels in the example region
(Horn of Africa)
are flagged in one or more months
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-region>`)
as suggested in the SPI comparison above,
although the flagged pixels do not always match one-to-one with the pixels that showed differences in SPI (compare Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial>`).

In [55]:
# Package probability and masks into dictionary for plotting function; note use of LaTeX instead of unicode/HTML symbols
probabilities = {r"$p_0$ (probability of zero precipitation)": [p_zero_era5drought, p_zero_reproduced],
                }
masks = {r"$p_0 > 0.33$": [p_zero_era5drought_033, p_zero_reproduced_033],
         r"$p_0 > 0.10$": [p_zero_era5drought_010, p_zero_reproduced_010],
         }

# Display quality flags – this step may take a few minutes
# Regional for tp1, for regional SPI comparison
plot_geospatial_comparison_quality_flags("tp1", probabilities=probabilities, masks=masks, example_month=12,
                                         shared_mask=LAND, domain=domain_region, flag_label=r"$p_0$",
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-region")

# Global for tp3 (comparable to SPEI-3 Shapiro–Wilk plot in Keune+25 Fig 3.
plot_geospatial_comparison_quality_flags("tp3", probabilities=probabilities, masks=masks, example_month=12,
                                         shared_mask=LAND, flag_label=r"$p_0$",
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-global")

::::{tab-set}
:::{tab-item} Global, 3-month
:sync: global
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-global
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-global"

Global probability of zero precipitation in the 3-month accumulation period and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
Probability is displayed for one calendar month (December) across the reference window (1991–2020).
Masks are displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
```
:::
:::{tab-item} Example region, 1-month
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-region
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-p0-region"

Probability of zero precipitation in the 1-month accumulation period and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
Probability is displayed for one calendar month (December) across the reference window (1991–2020).
Masks are displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
This figure displays only the example region (Horn of Africa), for comparison with
Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-geospatial>`.
```
:::
::::

#### 3.9 Quality flags: Shapiro–Wilk normality test
Another quality flag included in ERA5–Drought is the normality _α_,
derived using the Shapiro–Wilk test [[Shapiro+65](https://doi.org/10.1093/biomet/52.3-4.591)].
This _α_ quantifies how well the computed SPI or SPEI values
in the reference period
(1991–2020)
are described by a standard normal distribution.
As such, _α_ is provided for each combination of calendar month and accumulation window,
for each pixel.
The mask in ERA–Drought uses a threshold of 0.05, meaning points where _α_ < 0.05 are rejected.

In this subsection,
we reproduce the _α_ quality flag mask,
and compare its values to those provided in ERA5–Drought.
Because this involves computing SPI,
which is computationally expensive,
the evaluation is performed over the example region
(Horn of Africa)
rather than globally.

In [56]:
# Select only desired site
data_era5_precipitation_region = data_era5_precipitation_preprocessed.sel(**example_region)

# Calculate SPI
spi_reproduced_region = calculate_spi_from_era5(data_era5_precipitation_region, reference_window=reference_window,
                                                evaluation_window=reference_window)

In [57]:
# Apply Shapiro–Wilk normality test
normality_reproduced = shapiro_wilk_normality(spi_reproduced_region)
normality_reproduced.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Create mask from normality p-values
# True: above threshold, allowed
# False: below threshold, flagged
normality_reproduced_mask = (normality_reproduced >= 0.05)

# Display result
normality_reproduced_mask

<xarray.Dataset> Size: 792kB
Dimensions:  (month: 12, lat: 97, lon: 97)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPI1     (month, lat, lon) bool 113kB False False False ... True True True
    SPI3     (month, lat, lon) bool 113kB False False False ... True False False
    SPI6     (month, lat, lon) bool 113kB False False False ... False False
    SPI12    (month, lat, lon) bool 113kB True True False ... True True True
    SPI24    (month, lat, lon) bool 113kB True True True True ... True True True
    SPI36    (month, lat, lon) bool 113kB True True True ... True True True
    SPI48    (month, lat, lon) bool 113kB False True True ... True True True

The CDS provides ERA5–Drought's _α_ flag for each accumulation period,
but does not distinguish between them in the variable name.
This means that _α_ must be downloaded separately for each accumulation period, renamed, and merged together,
rather than downloading it for all simultaneously.
Note that unlike for _p{sub}`0`_,
ERA5–Drought does not provide the value of _α_, only the corresponding boolean mask.

In [58]:
# Setup: Request for each accumulation period
request_normality = {
    "variable": ["test_for_normality_spi"],
} | request_region | request_era5drought_flag

requests_per_accumulation_period = {period: {"accumulation_period": [str(period)],}
                                    for period in ACCUMULATION_PERIODS}

subrequests_era5drought_normality = {period: (req | request_normality)
                                       for period, req in requests_per_accumulation_period.items()}

# Download data in individual requests
normality_era5drought_mask = {period: ekd.from_source("cds", ID_ERA5_DROUGHT, subreq)  # Download as field lists
                              for period, subreq in subrequests_era5drought_normality.items()}

# Pre-process: Convert to xarray, handle variable names, month dimension
normality_era5drought_mask = preprocess_era5drought_qualityflag(normality_era5drought_mask, "SPI")
normality_era5drought_mask = normality_era5drought_mask.astype(bool)  # Convert to boolean array (values are only 0. or 1.)
normality_era5drought_mask.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display in notebook
normality_era5drought_mask

<xarray.Dataset> Size: 792kB
Dimensions:  (month: 12, lat: 97, lon: 97)
Coordinates:
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPI1     (month, lat, lon) bool 113kB True True True ... False False False
    SPI3     (month, lat, lon) bool 113kB True True True ... False False False
    SPI6     (month, lat, lon) bool 113kB False False False ... False False
    SPI12    (month, lat, lon) bool 113kB False False False ... False False
    SPI24    (month, lat, lon) bool 113kB False True False ... False False False
    SPI36    (month, lat, lon) bool 113kB True True True ... False False False
    SPI48    (month, lat, lon) bool 113kB False True True ... False False False
Attributes: (12/21)
    CDI:                     Climate Data Interface version 1.9.10 (https://m...
    Conventions:             CF-1.8
    source:                  DRYFALL v1.0
    institution:             European Centre for Medium-Range Weather Forecasts
    title:                   Quality criteria for the derived standardized dr...
    description:             Monthly quality criteria that define the reliabi...
    ...                      ...
    climate_end_date:        2020-12-31
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    CDO:                     Climate Data Operators version 1.9.10 (https://m...
    product_type:            Consolidated Dataset
    dataset_type:            Reanalysis

First,
we quantitatively compare how often the values of the normality mask desired from _α_ in ERA5–Drought and the reproduction match:

In [59]:
# Package probability and masks into dictionary for table function; note use unicode symbols / HTML
normality_flags = {"α < 0.05 [%]": [normality_reproduced_mask, normality_era5drought_mask],
                  }

# Compare probabilities per variable
compare_quality_flags(normality_flags, title_suffix=f" ({domain_region.name})")

,SPI-1,SPI-3,SPI-6,SPI-12,SPI-24,SPI-36,SPI-48
Matching α < 0.05 [%],74.83,84.23,87.91,92.21,90.39,90.06,88.80


The table above shows good agreement,
especially for longer accumulation periods.
For SPI-1, a quarter of the comparisons do not match.
While there are pixels across the entire region where _α_ does not match for one or two calendar months
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi1>`),
the majority of mismatches are concentrated in deserts (Sahara and Arabian peninsula),
which in practice would be masked anyway for failing the _p{sub}`0`_ test (see above).
This pattern is even stronger in the distribution of SPI-3 normality
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi3>`).
It is more difficult to fit a gamma distribution in drier areas and drier calendar months,
in which case SPI values are less trustworthy
– meaning the normality flag is working as intended.

In conclusion,
the differences in the normality mask (_α_ < 0.05) seen above are likely caused by the differences in fitted distributions seen before,
and thus do not affect the assessment of reproducibility.
The mask provided with ERA5–Drought can be used confidently to mask corresponding SPI values.

In [60]:
# Package masks into dictionary for plotting function; note use of LaTeX instead of unicode/HTML symbols
masks = {r"$\alpha < 0.05$": [normality_era5drought_mask, normality_reproduced_mask],
        }

# Display quality flags – this step may take a few minutes
# SPI-1: Compare to table
plot_geospatial_comparison_quality_flags("SPI1", masks=masks,
                                         shared_mask=LAND, domain=domain_region,
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi1")

# SPI-3: Compare to Keune+25 Fig 3.
plot_geospatial_comparison_quality_flags("SPI3", masks=masks,
                                         shared_mask=LAND, domain=domain_region,
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi3")

::::{tab-set}
:::{tab-item} SPI-1
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi1
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi1"

Shapiro–Wilk normality _α_ for SPI-1 and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
The _α_ < 0.05 mask is displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
This figure displays only the example region (Horn of Africa).
```
:::
:::{tab-item} SPI-3
:sync: spi3
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi3
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-normality-region-spi3"

Shapiro–Wilk normality _α_ for SPI-3 and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
The _α_ < 0.05 mask is displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
This figure displays only the example region (Horn of Africa).
```
:::
::::

(indicator_derived-drought-historical-monthly_consistency_q01:section-spei)=
### 4. SPEI comparison
The process of calculating SPEI is very similar to that for SPI, with three major differences:
* SPEI is based on the water balance (precipitation and potential evaporation or evapotranspiration), rather than just precipitation.
* SPEI is based on a logistic distribution, rather than a gamma distribution.
* SPEI does not need to be adjusted for months with zero precipitation.

As such, this section is structured similarly to [](indicator_derived-drought-historical-monthly_consistency_q01:section-spi) and can be run entirely independently, but some of the more detailed explanations from said section are left out for brevity this time.

#### 4.1 Download monthly precipitation and potential evaporation data from ERA5
First, the monthly-mean total precipitation (variable `228.128`) and evaporation (variable `251.228`) are downloaded from the [_Complete ERA5 global atmospheric reanalysis_](https://doi.org/10.24381/cds.143582cf) dataset.
More information about the format for these requests is available in the [MARS ERA5 catalogue](https://apps.ecmwf.int/data-catalogues/era5/?class=ea).

When executing this notebook yourself, if you have previously run [](indicator_derived-drought-historical-monthly_consistency_q01:section-spi) and have [caching](https://earthkit-data.readthedocs.io/en/latest/concepts/caching.html) enabled in earthkit-data, the downloaded precipitation data will be re-used.

In [61]:
request_era5_precipitation_moda = {
    "param": "228.128",  # Variable: Total precipitation
    "stream": "moda",    # Data stream: Monthly mean reanalysis
} | request_era5_template

request_era5_pev_moda = {
    "param": "251.228",  # Variable: Potential evaporation
    "stream": "moda",    # Data stream: Monthly mean reanalysis
} | request_era5_template

In [62]:
# Download data and load into xarray
data_era5_waterbalance_cds = ekd.from_source("cds", ID_ERA5, request_era5_precipitation_moda, request_era5_pev_moda)  # Download as field list
data_era5_waterbalance_cds = data_era5_waterbalance_cds.to_xarray(chunks={"valid_time": -1})  # Convert to xarray dataset, with Dask

# Pre-process to desired format
# Note the change in variable name
data_era5_waterbalance_preprocessed = preprocess_era5(data_era5_waterbalance_cds)

# Display in notebook
data_era5_waterbalance_preprocessed

  0%|          | 0/2 [00:00<?, ?it/s]

<xarray.Dataset> Size: 8GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
Data variables:
    tp       (time, lat, lon) float32 4GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    pev      (time, lat, lon) float32 4GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
Attributes:
    GRIB_centre:             ecmf
    GRIB_centreDescription:  European Centre for Medium-Range Weather Forecasts
    GRIB_subCentre:          0
    Conventions:             CF-1.7
    institution:             European Centre for Medium-Range Weather Forecasts

#### 4.2 Calculate water balance over accumulation periods
The water balance represents the net gain or loss of water in an area due to precipitation (gain) and evaporation (loss).
[ECMWF's convention](https://codes.ecmwf.int/grib/param-db/182), as used in ERA5, is that downward fluxes are positive and upward fluxes are negative.
This means that
total precipitation is always positive (or zero),
potential evaporation is always negative (or zero),
and the water balance is simply the sum of the two: _WB = TP + PEV_.

Here, we calculate the water balance per point in the downloaded ERA5 data and accumulate it over the same periods as before (1, 3, 6, 12, 24, 36, and 48 months).

The resulting accumulated time series for the example site defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup),
Addis Ababa in Ethiopia in our example,
are displayed in Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-wb-accumulated>`.
This example clearly demonstrates how the water balance moves between positive and negative
(net gain vs. net loss)
and how this changes depending on the accumulation period.
For example,
the shortest accumulation periods
(1–6 months)
swing up and down seasonally,
but the longer-term (e.g. 48-month) accumulated water balance tends to be positive except in specific periods (e.g. the 1960s).

In [63]:
# Calculate water balance
data_era5_waterbalance = calculate_waterbalance(data_era5_waterbalance_preprocessed)

# Accumulate water balance
data_era5_waterbalance = accumulate(data_era5_waterbalance, "wb")

# Display result
data_era5_waterbalance

<xarray.Dataset> Size: 59GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
Data variables:
    wb1      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb3      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb6      (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb12     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb24     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb36     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    wb48     (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>

In [64]:
# Display accumulated precipitation at example site
plot_accumulated_waterbalance(data_era5_waterbalance, example_site,
                              glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-wb-accumulated")

```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-wb-accumulated
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-wb-accumulated"

Water balance from ERA5 accumulated over different accumulation periods, for the example site of Addis Ababa, Ethiopia.
```

#### 4.3 Fit logistic distribution and compute SPEI
While SPI assumes a gamma distribution for total precipitation,
this does not hold for water balance.
For SPEI,
various distributions are used in the literature [[Stagge+15](https://doi.org/10.1002/joc.4267)].
While [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] specifies that ERA5–Drought's SPEI is based on the generalised log-logistic distribution,
following [[Vicente-Serrano+10](https://doi.org/10.1175/2009JCLI2909.1)],
private communication with the authors indicates that a generalised logistic distribution is used instead.

As before, the distribution is fitted to data in the reference window (1991–2020),
Here, we use
[scipy.stats.genlogistic](https://docs.scipy.org/doc/scipy/reference/generated/scipy.stats.genlogistic.html)
to fit the generalised logistic distribution.
This returns three parameters for each calendar month and accumulation period, namely
shape (_c_), location (_μ_), and scale (_β_).

The observed (accumulated) water balance values along the entire time series
are then compared to the fitted parameters in terms of where they fall on the cumulative distribution function (CDF).
From these CDF values,
SPEI values
for each data point (latitude, longitude, time)
are calculated by transforming to a standard normal distribution.
The zero-precipitation correction from [](indicator_derived-drought-historical-monthly_consistency_q01:section-spi) is not relevant to SPEI.

Note that actually evaluating the CDF
– as opposed to [queueing it up in dask](https://docs.xarray.dev/en/stable/user-guide/dask.html), as done here –
can be slow, especially for a large dataset like global ERA5 precipitation and evaporation.
As such, if you are interested in a subset of the data,
such as a specific site or period in time,
it may be best to subset your data _before_ calculating the CDF rather than afterwards.
An example of this is provided below in the comparison with ERA5–Drought SPEI.

In [65]:
# Select data in reference window
data_era5_waterbalance_reference = data_era5_waterbalance.sel(**reference_window)

# Fit generalised logistic distribution
spei_parameters = fit_monthly_spei(data_era5_waterbalance_reference)

# Compute CDF time series
cdf = compute_cdf_spei(data_era5_waterbalance, spei_parameters)

# Calculate SPI from adjusted CDF
spei_reproduced = cdf_to_spei(cdf)

# Display result
spei_reproduced

<xarray.Dataset> Size: 59GB
Dimensions:  (time: 1020, lat: 721, lon: 1440)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
    month    (time) int64 8kB dask.array<chunksize=(1020,), meta=np.ndarray>
Data variables:
    SPEI1    (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI3    (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI6    (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI12   (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI24   (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI36   (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>
    SPEI48   (time, lat, lon) float64 8GB dask.array<chunksize=(1020, 103, 360), meta=np.ndarray>

#### 4.4 SPEI comparison: Time series in example site
Having reproduced SPEI from ERA5 precipitation and potential evaporation data following the ERA5–Drought methodology,
we can now compare the results to assess the reproducibility of ERA5–Drought.
We first compare the datasets over time at the example site defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).

As before,
because the global calculation set up in the previous subsections can take a long time to execute,
here we sub-select the downloaded ERA5 data and calculate SPEI for the example site only.
For convenience, the full SPEI pipeline is wrapped into a single `calculate_spei_from_era5` function,
as defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup).

In [66]:
# Select only desired site
data_era5_waterbalance_site = data_era5_waterbalance_preprocessed.sel(**example_site)
data_era5_waterbalance_site.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Calculate SPEI
spei_reproduced_site = calculate_spei_from_era5(data_era5_waterbalance_site, reference_window=reference_window)

# Display result
spei_reproduced_site

<xarray.Dataset> Size: 73kB
Dimensions:  (time: 1020)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
    lat      float64 8B 9.0
    lon      float64 8B 38.75
    month    (time) int64 8kB 1 2 3 4 5 6 7 8 9 10 11 ... 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPEI1    (time) float64 8kB 0.6565 2.343 1.629 0.7559 ... 2.48 1.465 -1.157
    SPEI3    (time) float64 8kB nan nan 2.608 2.049 ... 1.689 1.672 2.351
    SPEI6    (time) float64 8kB nan nan nan nan ... -0.6899 0.08524 1.025 1.617
    SPEI12   (time) float64 8kB nan nan nan nan ... -0.4602 0.3764 0.4592 0.4688
    SPEI24   (time) float64 8kB nan nan nan nan nan ... 1.38 1.953 1.89 1.888
    SPEI36   (time) float64 8kB nan nan nan nan ... 0.4423 0.8694 1.014 1.067
    SPEI48   (time) float64 8kB nan nan nan nan ... 0.03207 0.639 0.7308 0.7452

Next, we download the corresponding data from ERA5–Drought.
Because of size limits on the CDS,
the time series must be downloaded in parts:

In [67]:
# Main request, based on template and example site
request_era5drought_spei = {
    "variable": ["standardised_precipitation_evapotranspiration_index"],
} | request_era5drought_index | request_site

# Split into batches of up to 20 years each
subrequests_era5drought_spei = batch_requests(request_era5drought_spei, n=20)

# Download data and load into xarray
spei_era5drought_site = ekd.from_source("cds", ID_ERA5_DROUGHT, *subrequests_era5drought_spei)
spei_era5drought_site = spei_era5drought_site.to_xarray(compat="equals", join="outer")
spei_era5drought_site.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Select only desired site (remove margins)
spei_era5drought_site = spei_era5drought_site.sel(**example_site)

# Display result
spei_era5drought_site

  0%|          | 0/5 [00:00<?, ?it/s]

<xarray.Dataset> Size: 65kB
Dimensions:  (time: 1020)
Coordinates:
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
    lat      float64 8B 9.0
    lon      float64 8B 38.75
Data variables:
    SPEI12   (time) float64 8kB nan nan nan nan ... -0.4163 0.411 0.4928 0.5002
    SPEI1    (time) float64 8kB 0.6565 2.304 1.592 0.7688 ... 2.445 1.432 -1.144
    SPEI24   (time) float64 8kB nan nan nan nan nan ... 1.356 1.873 1.833 1.815
    SPEI36   (time) float64 8kB nan nan nan nan ... 0.4986 0.9954 1.146 1.218
    SPEI3    (time) float64 8kB nan nan 2.631 2.001 ... 1.63 1.631 2.301
    SPEI48   (time) float64 8kB nan nan nan nan ... 0.08636 0.6883 0.7797 0.7959
    SPEI6    (time) float64 8kB nan nan nan nan ... -0.6537 0.1451 1.029 1.557
Attributes: (12/19)
    title:                   SPEI12
    description:             Drought Index: Standardized Drought Index calcul...
    Conventions:             CF-1.8
    history:                 Created 13/08/2024 14:50:12 using DRYFALL.
    institution:             European Centre for Medium-Range Weather Forecasts
    source:                  DRYFALL v1.0
    ...                      ...
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    ref_publication:         Keune, J., Di Giuseppe, F., Barnard, C., Damasio...
    cds_data_catalogue_url:  https://cds.climate.copernicus.eu/datasets/deriv...
    product_type:            Reanalysis
    dataset_type:            Consolidated dataset

Again, we examine the per-point difference in SPEI between ERA5–Drought and the reproduction for each calendar month and each accumulation period.
We calculate the median difference MΔ and median absolute difference M|Δ|,
as well as the percentage of match-ups where |Δ| ≥ 0.10:

In [68]:
# Calculate SPEI median differences
spei_difference_site = comparison_monthly_statistics(spei_era5drought_site, spei_reproduced_site)

# Display with style
display_monthly_statistics(spei_difference_site)

At first glance, agreement in SPEI is considerably worse than in SPI.
This shows in non-zero median and median absolute differences for most calendar month–accumulation period pairs,
as well as larger percentages of match-ups that exceed the threshold of 0.10 difference.
These patterns are visible in the time series comparison
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries>`)
in the form of noticeable scatter about the 0-line,
in addition to a few spikes like those seen in
Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries>`.

However,
agreement is still good in general,
and the discrepancies seen above rarely lead to differences in classification
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion>`).
This is particularly important for SPEI-36,
where differences in 1950–1970 are large but do not change the resulting classification.

The most likely cause for the increased difference is the choice of statistical distribution.
As noted above,
it is not entirely clear which distribution underpins ERA5–Drought's SPEI values,
and the
[scipy.stats.genlogistic](https://docs.scipy.org/doc/scipy/reference/generated/scipy.stats.genlogistic.html)
implementation used in this notebook may not be the same one.
For example,
[Wikipedia](https://en.wikipedia.org/wiki/Generalized_logistic_distribution)
lists four different _generalised logistic_ distributions.
If the distribution used in ERA5–Drought is not equal to, but similar to, the implementation used in this notebook,
that may well result in consistent, small differences in the exact values but good agreement overall
– as seen in this analysis.

In [69]:
# Plot time series comparison (absolute values and differences)
plot_time_series_comparison_spei(spei_era5drought_site, spei_reproduced_site, title_suffix=f" at {label_site}",
                                 glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries")

In [70]:
# Plot confusion matrix comparison
# e.g. are all "extremely dry" data in ERA5–Drought also "extremely dry" in the reproduction?
plot_confusion_matrices_spei(spei_era5drought_site, spei_reproduced_site, title_suffix=f" at {label_site}",
                             glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion")

::::{tab-set}
:::{tab-item} Time series
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
```
:::
:::{tab-item} Confusion matrix
:sync: confusion
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion"

Confusion matrices for SPEI categories from ERA5–Drought vs. reproduced from ERA5, for the example site of Addis Ababa, Ethiopia, in 1940–2024.
```
:::
::::

#### 4.5 SPEI comparison: Regional snapshot
Next, we investigate spatial patterns in SPEI and the difference therein across a wider region around the example site.
This region is defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).
In this example, we look at part of the Horn of Africa using a box of 12° in all directions around Addis Ababa, Ethiopia.
To reduce computing requirements, the comparison is performed for one year only,
here 2024, again defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-general_setup).

As in the time series comparison,
we subselect the desired data from ERA5 and calculate the corresponding SPEI
and
download SPEI from ERA5–Drought for the desired region and time span:

In [71]:
# Select only desired region
data_era5_waterbalance_region = data_era5_waterbalance_preprocessed.sel(**example_region)
data_era5_waterbalance_region.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Window in which to evaluate SPEI
evaluation_window = {"time": slice(f"{year_snapshot}-01-01", f"{year_snapshot}-12-01")}  #  Slice (2024-01-01, 2024-12-01)

# Calculate SPEI – this step may take a long time, up to several hours, depending on computing resources available
spei_reproduced_region = calculate_spei_from_era5(data_era5_waterbalance_region, reference_window=reference_window,
                                                  evaluation_window=evaluation_window)

# Display result
spei_reproduced_region

<xarray.Dataset> Size: 6MB
Dimensions:  (time: 12, lat: 97, lon: 97)
Coordinates:
    number   int64 8B 0
  * time     (time) datetime64[ns] 96B 2024-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
    month    (time) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPEI1    (time, lat, lon) float64 903kB -0.1407 -0.159 ... 0.3726 0.3776
    SPEI3    (time, lat, lon) float64 903kB -1.196 -1.191 ... -0.392 -0.3943
    SPEI6    (time, lat, lon) float64 903kB -2.28 -2.277 ... -0.03529 0.06133
    SPEI12   (time, lat, lon) float64 903kB -0.9552 -0.9675 ... 1.223 1.338
    SPEI24   (time, lat, lon) float64 903kB -1.413 -1.404 -1.313 ... 2.21 2.209
    SPEI36   (time, lat, lon) float64 903kB -2.041 -1.853 -1.421 ... 1.538 1.548
    SPEI48   (time, lat, lon) float64 903kB -1.577 -1.435 ... 1.132 1.148

In [72]:
# Main request, based on template and example region
request_era5drought_spei = {
    "variable": ["standardised_precipitation_evapotranspiration_index"],
} | request_era5drought_index | request_region

# Select only desired year
request_era5drought_spei = request_era5drought_spei | {"year": [f"{year_snapshot}"],}

# Download data and load into xarray
spei_era5drought_region = ekd.from_source("cds", ID_ERA5_DROUGHT, request_era5drought_spei)
spei_era5drought_region = spei_era5drought_region.to_xarray(compat="equals", join="outer")
spei_era5drought_region.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display result
spei_era5drought_region

<xarray.Dataset> Size: 6MB
Dimensions:  (time: 12, lat: 97, lon: 97)
Coordinates:
  * time     (time) datetime64[ns] 96B 2024-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
Data variables:
    SPEI12   (time, lat, lon) float64 903kB -0.9552 -0.9676 -0.8547 ... nan nan
    SPEI1    (time, lat, lon) float64 903kB -0.1407 -0.159 -0.2057 ... nan nan
    SPEI24   (time, lat, lon) float64 903kB -1.414 -1.404 -1.313 ... nan nan nan
    SPEI36   (time, lat, lon) float64 903kB -2.039 -1.854 -1.42 ... nan nan nan
    SPEI3    (time, lat, lon) float64 903kB -1.196 -1.191 -0.6366 ... nan nan
    SPEI48   (time, lat, lon) float64 903kB -1.577 -1.436 -0.9544 ... nan nan
    SPEI6    (time, lat, lon) float64 903kB -2.279 -2.277 -1.663 ... nan nan nan
Attributes: (12/19)
    title:                   SPEI12
    description:             Drought Index: Standardized Drought Index calcul...
    Conventions:             CF-1.8
    history:                 Created 30/10/2024 07:49:35 using DRYFALL.
    institution:             European Centre for Medium-Range Weather Forecasts
    source:                  DRYFALL v1.0
    ...                      ...
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    ref_publication:         Keune, J., Di Giuseppe, F., Barnard, C., Damasio...
    cds_data_catalogue_url:  https://cds.climate.copernicus.eu/datasets/deriv...
    product_type:            Reanalysis
    dataset_type:            Consolidated dataset

As before,
we examine the per-point difference in SPI between ERA5–Drought and the reproduction for each calendar month and each accumulation period:

In [73]:
# Calculate SPEI median differences
spei_difference_region = comparison_monthly_statistics(spei_era5drought_region, spei_reproduced_region)

# Display with style
display_monthly_statistics(spei_difference_region)

The regional comparison between ERA5–Drought and reproduced SPEI largely shows the same patterns as the time series comparison.
Across most calendar months and accumulation periods,
the differences are bigger than for SPI,
although there are exceptions like January–March in SPI/SPEI-1.
This may be related to the local dry season [[Gebrechorkos+19](https://doi.org/10.1038/s41598-019-47933-8)],
which would affect SPI more by introducting zero- or low-precipitation months,
or may be a coincidence.
Overall, agreement in SPEI is good.

Differences between the two datasets tend to concentrate in the same areas across accumulation periods,
particularly the Sudan–South Sudan–Ethiopia tri-country area
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-geospatial>`).
It is unclear whether this pattern is meaningful,
considering the potential difference in statistical distribution between the datasets.
The largest differences tend to occur in extremely wet or extremely dry conditions,
and tend not to affect the resulting classification
(Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion-region>`).

In [74]:
plot_geospatial_comparison(spei_era5drought_region, spei_reproduced_region, var="SPEI", time=f"{year_snapshot}-12-01",
                           domain=domain_region,
                           glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-geospatial")

In [75]:
# Plot confusion matrix comparison
# e.g. are all "extremely dry" data in ERA5–Drought also "extremely dry" in the reproduction?
plot_confusion_matrices_spei(spei_era5drought_region, spei_reproduced_region, title_suffix=f" in {label_region}",
                             glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion-region")

::::{tab-set}
:::{tab-item} Geospatial
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-geospatial
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-geospatial"

SPEI downloaded from ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference between the two (right), for the region around the example site of Addis Ababa, Ethiopia.
Only one month (December 2024) is displayed.
Colours correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
```
:::
:::{tab-item} Confusion matrix
:sync: confusion
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion-region
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-confusion-region"

Confusion matrices for SPEI categories from ERA5–Drought vs. reproduced from ERA5, across the region around the example site of Addis Ababa, Ethiopia.
Combines data for all months within one year (2024).
```
:::
::::

#### 4.6 Quality flags: Shapiro–Wilk normality test
ERA5–Drought includes one quality flag for SPEI, namely the normality _α_,
derived using the Shapiro–Wilk test [[Shapiro+65](https://doi.org/10.1093/biomet/52.3-4.591)].
This _α_ quantifies how well the computed SPI or SPEI values
in the reference period
(1991–2020)
are described by a standard normal distribution.
As such, _α_ is provided for each combination of calendar month and accumulation window,
for each pixel.
The mask in ERA–Drought uses a threshold of 0.05, meaning points where _α_ < 0.05 are rejected.

In this subsection,
we reproduce the _α_ quality flag mask,
and compare its values to those provided in ERA5–Drought.
Because this involves computing SPEI,
which is computationally expensive,
the evaluation is performed over the example region
(Horn of Africa)
rather than globally.

In [76]:
# Select only desired site
data_era5_waterbalance_region = data_era5_waterbalance_preprocessed.sel(**example_region)

# Calculate SPEI
spei_reproduced_region = calculate_spei_from_era5(data_era5_waterbalance_region, reference_window=reference_window,
                                                  evaluation_window=reference_window)

In [77]:
# Apply Shapiro–Wilk normality test
normality_reproduced = shapiro_wilk_normality(spei_reproduced_region)
normality_reproduced.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Create mask from normality p-values
# True: above threshold, allowed
# False: below threshold, flagged
normality_reproduced_mask = (normality_reproduced >= 0.05)

# Display result
normality_reproduced_mask

<xarray.Dataset> Size: 792kB
Dimensions:  (month: 12, lat: 97, lon: 97)
Coordinates:
    number   int64 8B 0
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPEI1    (month, lat, lon) bool 113kB True True False ... True True True
    SPEI3    (month, lat, lon) bool 113kB True True True ... False False False
    SPEI6    (month, lat, lon) bool 113kB True True True ... True True True
    SPEI12   (month, lat, lon) bool 113kB True True True ... True True False
    SPEI24   (month, lat, lon) bool 113kB True True True True ... True True True
    SPEI36   (month, lat, lon) bool 113kB True True True True ... True True True
    SPEI48   (month, lat, lon) bool 113kB False False True ... True True True

The CDS provides ERA5–Drought's _α_ flag for each accumulation period,
but does not distinguish between them in the variable name.
This means that _α_ must be downloaded separately for each accumulation period, renamed, and merged together,
rather than downloading it for all simultaneously.
Note that unlike for _p{sub}`0`_,
ERA5–Drought does not provide the value of _α_, only the corresponding boolean mask.

In [78]:
# Setup: Request for each accumulation period
request_normality = {
    "variable": ["test_for_normality_spei"],
} | request_region | request_era5drought_flag

requests_per_accumulation_period = {period: {"accumulation_period": [str(period)],}
                                    for period in ACCUMULATION_PERIODS}

subrequests_era5drought_normality = {period: (req | request_normality)
                                       for period, req in requests_per_accumulation_period.items()}

# Download data in individual requests
normality_era5drought_mask = {period: ekd.from_source("cds", ID_ERA5_DROUGHT, subreq)  # Download as field lists
                              for period, subreq in subrequests_era5drought_normality.items()}

# Pre-process: Convert to xarray, handle variable names, month dimension
normality_era5drought_mask = preprocess_era5drought_qualityflag(normality_era5drought_mask, "SPEI")
normality_era5drought_mask = normality_era5drought_mask.astype(bool)  # Convert to boolean array (values are only 0. or 1.)
normality_era5drought_mask.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Display in notebook
normality_era5drought_mask

<xarray.Dataset> Size: 792kB
Dimensions:  (month: 12, lat: 97, lon: 97)
Coordinates:
  * lon      (lon) float64 776B 26.75 27.0 27.25 27.5 ... 50.0 50.25 50.5 50.75
  * lat      (lat) float64 776B 21.0 20.75 20.5 20.25 ... -2.25 -2.5 -2.75 -3.0
  * month    (month) int64 96B 1 2 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPEI1    (month, lat, lon) bool 113kB True True False ... False False False
    SPEI3    (month, lat, lon) bool 113kB True True True ... False False False
    SPEI6    (month, lat, lon) bool 113kB True True True ... False False False
    SPEI12   (month, lat, lon) bool 113kB True True True ... False False False
    SPEI24   (month, lat, lon) bool 113kB True True True ... False False False
    SPEI36   (month, lat, lon) bool 113kB True True True ... False False False
    SPEI48   (month, lat, lon) bool 113kB False False True ... False False False
Attributes: (12/21)
    CDI:                     Climate Data Interface version 1.9.10 (https://m...
    Conventions:             CF-1.8
    source:                  DRYFALL v1.0
    institution:             European Centre for Medium-Range Weather Forecasts
    title:                   Quality criteria for the derived standardized dr...
    description:             Monthly quality criteria that define the reliabi...
    ...                      ...
    climate_end_date:        2020-12-31
    frequency:               Monthly
    contact_person:          support@ecmwf.int
    CDO:                     Climate Data Operators version 1.9.10 (https://m...
    product_type:            Consolidated Dataset
    dataset_type:            Reanalysis

First,
we quantitatively compare how often the values of the normality mask desired from _α_ in ERA5–Drought and the reproduction match:

In [79]:
# Package probability and masks into dictionary for table function; note use unicode symbols / HTML
normality_flags = {"α < 0.05 [%]": [normality_reproduced_mask, normality_era5drought_mask],
                  }
        
# Compare probabilities per variable
compare_quality_flags(normality_flags, title_suffix=f" ({domain_region.name})")

,SPEI-1,SPEI-3,SPEI-6,SPEI-12,SPEI-24,SPEI-36,SPEI-48
Matching α < 0.05 [%],92.77,91.43,90.64,91.13,88.83,87.77,87.51


Agreement in the SPEI normality flag is excellent
(≥87%)
across all accumulation periods.
The normality mask is applied much more rarely for SPEI than for SPI
and mismatched months appear randomly distributed across the Horn region
(Figures
{numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei1>`
and
{numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei3>`).
This result shows that while the fitted distributions themselves may differ between ERA5–Drought and the reproduction,
they tend to either both pass or both fail the normality test.

In [80]:
# Package masks into dictionary for plotting function; note use of LaTeX instead of unicode/HTML symbols
masks = {r"$\alpha < 0.05$": [normality_era5drought_mask, normality_reproduced_mask],
        }

# Display quality flags – this step may take a few minutes
# SPI-1: Compare to table
plot_geospatial_comparison_quality_flags("SPEI1", masks=masks,
                                         shared_mask=LAND, domain=domain_region,
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei1")

# SPI-3: Compare to Keune+25 Fig 3.
plot_geospatial_comparison_quality_flags("SPEI3", masks=masks,
                                         shared_mask=LAND, domain=domain_region,
                                         glue_label="indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei3")

::::{tab-set}
:::{tab-item} SPEI-1
:sync: timeseries
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei1
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei1"

Shapiro–Wilk normality _α_ for SPEI-1 and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
The _α_ < 0.05 mask is displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
This figure displays only the example region (Horn of Africa).
```
:::
:::{tab-item} SPEI-3
:sync: spi3
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei3
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-normality-region-spei3"

Shapiro–Wilk normality _α_ for SPEI-3 and associated masks in ERA5–Drought (left) vs. reproduced from ERA5 precipitation data (middle) and the difference or mismatch between the two (right).
The _α_ < 0.05 mask is displayed as the number of calendar months that get flagged and the oceans are masked,
following [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] Fig. 3.
This figure displays only the example region (Horn of Africa).
```
:::
::::

(indicator_derived-drought-historical-monthly_consistency_q01:section-ensemble)=
### 5. Ensemble comparison
One of the key strengths of ERA5–Drought is its inclusion of 10 ensemble members,
propagated from ERA5,
which can be used to probe
(part of)
the uncertainty in SPI and SPEI values [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].

Here, we briefly demonstrate the reproducibility of the ERA5–Drought ensemble from the corresponding ERA5 ensemble members.
To avoid repetition
and
reduce computational cost
– since the ensemble dataset is 10× the size of the reanalysis –
this section focuses on the case study of
SPI and SPEI in one site.
If you are keen to investigate the reproducibility of the ERA5–Drought ensemble more,
the code provided in this notebook can easily be re-used to do so.

#### 5.1 Compute SPI and SPEI from ERA5 ensemble

As before,
precipitation and potential evaporation are downloaded from
the [_Complete ERA5 global atmospheric reanalysis_](https://doi.org/10.24381/cds.143582cf) dataset,
but this time using the `edmo` (monthly ensemble) stream.
The ERA5 ensemble is provided at a coarser resolution than the main reanalysis;
ERA5–Drought regrids both to the same 0.25° by 0.25° grid,
which we do here using MARS's internal functionalities.
In code, this is implemented through the line
`"grid": "0.25/0.25",`
in the ERA5 request (`request_era5_template`).

In [81]:
# Setup: Parameters, batched requests
params_edmo = ["228.128", "251.228",] # Total precipitation, Total potential evaporation
number_batches_edmo = ["0/1/2", "3/4/5/6/7/8/9",]  # Split ensemble into batches to avoid rate limits
# (there is no deliberate logic in splitting into 0..2 and 3..9 rather than more equal batches)

# Generate requests: First the EDMO-specific component, then the full request
requests_era5_edmo = [{"param": param, "number": number_batch, "stream": "edmo"}
                      for param in params_edmo
                      for number_batch in number_batches_edmo
                     ]
requests_era5_edmo = [request_era5_template | req for req in requests_era5_edmo]

# Download data and load into xarray
data_era5_waterbalance_ensemble_cds = ekd.from_source("cds", ID_ERA5, *requests_era5_edmo)  # Download as field list
data_era5_waterbalance_ensemble_cds = data_era5_waterbalance_ensemble_cds.to_xarray(chunks={"number": 1, "valid_time": -1}, compat="equals")

# Pre-process to desired format
# Note the change in variable name
data_era5_waterbalance_ensemble_preprocessed = preprocess_era5(data_era5_waterbalance_ensemble_cds)

# Display in notebook
data_era5_waterbalance_ensemble_preprocessed 

  0%|          | 0/4 [00:00<?, ?it/s]

<xarray.Dataset> Size: 85GB
Dimensions:  (number: 10, time: 1020, lat: 721, lon: 1440)
Coordinates:
  * number   (number) int64 80B 0 1 2 3 4 5 6 7 8 9
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
  * lat      (lat) float64 6kB 90.0 89.75 89.5 89.25 ... -89.5 -89.75 -90.0
  * lon      (lon) float64 12kB -180.0 -179.8 -179.5 ... 179.2 179.5 179.8
Data variables:
    tp       (number, time, lat, lon) float32 42GB dask.array<chunksize=(1, 1020, 103, 360), meta=np.ndarray>
    pev      (number, time, lat, lon) float32 42GB dask.array<chunksize=(1, 1020, 103, 360), meta=np.ndarray>
Attributes:
    GRIB_centre:             ecmf
    GRIB_centreDescription:  European Centre for Medium-Range Weather Forecasts
    GRIB_subCentre:          0
    Conventions:             CF-1.7
    institution:             European Centre for Medium-Range Weather Forecasts

SPI and SPEI are calculated using the
`calculate_spi_from_era5` and `calculate_spei_from_era5`
functions defined in [](indicator_derived-drought-historical-monthly_consistency_q01:section-code_setup).
These functions handle the ensemble members,
which are stored along a separate dimension,
by applying the full SPI / SPEI pipeline to each member independently,
just like in ERA5–Drought.

In [82]:
# Select only desired site
data_era5_waterbalance_ensemble_preprocessed_site = data_era5_waterbalance_ensemble_preprocessed.sel(**example_site)
data_era5_waterbalance_ensemble_preprocessed_site.load()  # Persist in memory to speed up analysis – this step may take a few minutes

# Calculate SPI for example site, for all members
spi_reproduced_site_ensemble  = calculate_spi_from_era5(data_era5_waterbalance_ensemble_preprocessed_site,
                                                       reference_window=reference_window)

# Calculate SPEI for example site, for all members
spei_reproduced_site_ensemble = calculate_spei_from_era5(data_era5_waterbalance_ensemble_preprocessed_site,
                                                         reference_window=reference_window)

# Display result
spei_reproduced_site_ensemble

<xarray.Dataset> Size: 588kB
Dimensions:  (number: 10, time: 1020)
Coordinates:
  * number   (number) int64 80B 0 1 2 3 4 5 6 7 8 9
  * time     (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01T06:...
    lat      float64 8B 9.0
    lon      float64 8B 38.75
    month    (time) int64 8kB 1 2 3 4 5 6 7 8 9 10 11 ... 3 4 5 6 7 8 9 10 11 12
Data variables:
    SPEI1    (number, time) float64 82kB 0.3927 1.716 2.345 ... 0.8785 -1.587
    SPEI3    (number, time) float64 82kB nan nan 2.478 ... 1.741 1.916 1.579
    SPEI6    (number, time) float64 82kB nan nan nan nan ... 1.107 1.824 1.655
    SPEI12   (number, time) float64 82kB nan nan nan ... 0.8807 0.8563 0.8725
    SPEI24   (number, time) float64 82kB nan nan nan nan ... 2.572 2.675 2.517
    SPEI36   (number, time) float64 82kB nan nan nan nan ... 1.187 1.284 1.349
    SPEI48   (number, time) float64 82kB nan nan nan ... 0.9139 0.9423 0.9647

There is a slight difference between ERA5 and ERA5–Drought in terms of the format of the ensemble.
For ERA5, the ensemble members are arranged along the `number` direction, going from 0 to 9.
For ERA5–Drought, it is the `realization` dimension, from 1 to 10.
To be able to compare the two datasets,
we add a matching `realization` dimension to the SPI / SPEI values derived from ERA5 above:

In [83]:
# Convert ensemble dimension
spi_reproduced_site_ensemble  = number_to_ensemble_dimension(spi_reproduced_site_ensemble)
spei_reproduced_site_ensemble = number_to_ensemble_dimension(spei_reproduced_site_ensemble)

# Display result
spei_reproduced_site_ensemble

<xarray.Dataset> Size: 588kB
Dimensions:      (realization: 10, time: 1020)
Coordinates:
    number       (realization) int64 80B 0 1 2 3 4 5 6 7 8 9
  * time         (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01...
    lat          float64 8B 9.0
    lon          float64 8B 38.75
    month        (time) int64 8kB 1 2 3 4 5 6 7 8 9 10 ... 4 5 6 7 8 9 10 11 12
  * realization  (realization) int64 80B 1 2 3 4 5 6 7 8 9 10
Data variables:
    SPEI1        (realization, time) float64 82kB 0.3927 1.716 ... 0.8785 -1.587
    SPEI3        (realization, time) float64 82kB nan nan 2.478 ... 1.916 1.579
    SPEI6        (realization, time) float64 82kB nan nan nan ... 1.824 1.655
    SPEI12       (realization, time) float64 82kB nan nan nan ... 0.8563 0.8725
    SPEI24       (realization, time) float64 82kB nan nan nan ... 2.675 2.517
    SPEI36       (realization, time) float64 82kB nan nan nan ... 1.284 1.349
    SPEI48       (realization, time) float64 82kB nan nan nan ... 0.9423 0.9647

#### 5.2 Download SPI and SPEI ensembles from ERA5–Drought
Next, we download the SPI and SPEI ensemble data from ERA5–Drought.

In [84]:
# Main request, based on template and example site
request_era5drought_spi_ensemble = {
    "variable": ["standardised_precipitation_index"],
} | request_era5drought_index_ensemble | request_site

request_era5drought_spei_ensemble = {
    "variable": ["standardised_precipitation_evapotranspiration_index"],
} | request_era5drought_index_ensemble | request_site

# Split into batches per accumulation period
subrequests_era5drought_spi_ensemble  = batch_requests(request_era5drought_spi_ensemble,  batch_key="accumulation_period", n=1)
subrequests_era5drought_spei_ensemble = batch_requests(request_era5drought_spei_ensemble, batch_key="accumulation_period", n=1)

In [85]:
# Download SPI data and load into xarray
spi_era5drought_site_ensemble = ekd.from_source("cds", ID_ERA5_DROUGHT, *subrequests_era5drought_spi_ensemble)
spi_era5drought_site_ensemble = spi_era5drought_site_ensemble.to_xarray(compat="equals")  # Convert to xarray dataset

# Download SPEI data and load into xarray
spei_era5drought_site_ensemble = ekd.from_source("cds", ID_ERA5_DROUGHT, *subrequests_era5drought_spei_ensemble)
spei_era5drought_site_ensemble = spei_era5drought_site_ensemble.to_xarray(compat="equals")  # Convert to xarray dataset

# Load into memory without dask, since this is a small amount of data
spi_era5drought_site_ensemble.load()
spei_era5drought_site_ensemble.load()

# Select only desired site (remove margins)
spi_era5drought_site_ensemble  =  spi_era5drought_site_ensemble.sel(**example_site)
spei_era5drought_site_ensemble = spei_era5drought_site_ensemble.sel(**example_site)

# Display result
spei_era5drought_site_ensemble

  0%|          | 0/7 [00:00<?, ?it/s]

  0%|          | 0/7 [00:00<?, ?it/s]

<xarray.Dataset> Size: 579kB
Dimensions:      (time: 1020, realization: 10)
Coordinates:
  * time         (time) datetime64[ns] 8kB 1940-01-01T06:00:00 ... 2024-12-01...
  * realization  (realization) int32 40B 1 2 3 4 5 6 7 8 9 10
    lat          float64 8B 9.0
    lon          float64 8B 38.75
Data variables:
    SPEI1        (time, realization) float64 82kB 0.3927 0.009927 ... -1.574
    SPEI3        (time, realization) float64 82kB nan nan nan ... 0.9642 1.547
    SPEI6        (time, realization) float64 82kB nan nan nan ... 0.8647 1.835
    SPEI12       (time, realization) float64 82kB nan nan nan ... 0.5686 0.9275
    SPEI24       (time, realization) float64 82kB nan nan nan ... 1.854 2.946
    SPEI36       (time, realization) float64 82kB nan nan nan ... 1.162 1.541
    SPEI48       (time, realization) float64 82kB nan nan nan ... 0.7052 1.072
Attributes: (12/21)
    CDI:                     Climate Data Interface version 1.9.10 (https://m...
    Conventions:             CF-1.8
    source:                  DRYFALL v1.0
    institution:             European Centre for Medium-Range Weather Forecasts
    title:                   SPEI1
    description:             Drought Index: Standardized Drought Index calcul...
    ...                      ...
    contact_person:          support@ecmwf.int
    CDO:                     Climate Data Operators version 1.9.10 (https://m...
    ref_publication:         Keune, J., Di Giuseppe, F., Barnard, C., Damasio...
    cds_data_catalogue_url:  https://cds.climate.copernicus.eu/datasets/deriv...
    product_type:            Ensemble Members
    dataset_type:            Consolidated dataset

#### 5.3 Ensemble comparison: Time series in example site

As before,
we examine the per-point difference in SPI and SPEI between ERA5–Drought and the reproduction for each calendar month and each accumulation period.

##### Control member
First, we compare ERA5–Drought and the reproduction for the first ensemble member only.
This member is the control,
initialised with the same conditions as the main reanalysis
(which was analysed in the previous sections)
but run at the reduced resolution of the ERA5-EDA ensemble [[Hersbach+20](https://doi.org/10.1002/qj.3803)]
and then regridded to 0.25° by 0.25° in ERA5–Drought [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].

In [86]:
# Calculate SPI median differences
spi_difference_site_onemember = comparison_monthly_statistics(spi_era5drought_site_ensemble.sel({ENSEMBLE_DIMENSION: 1}),
                                                              spi_reproduced_site_ensemble.sel({ENSEMBLE_DIMENSION: 1}))

# Display with style
display_monthly_statistics(spi_difference_site_onemember)

In [87]:
# Calculate SPEI median differences
spei_difference_site_onemember = comparison_monthly_statistics(spei_era5drought_site_ensemble.sel({ENSEMBLE_DIMENSION: 1}),
                                                               spei_reproduced_site_ensemble.sel({ENSEMBLE_DIMENSION: 1}))

# Display with style
display_monthly_statistics(spei_difference_site_onemember)

The control-member comparisons for SPI and SPEI look very similar to the reanalysis comparisons from previous sections.
Given these similarities,
it is therefore fair to conclude that the ensemble and reanalysis components of ERA5–Drought are equally reproducible from ERA5.

##### Full ensemble
Next, we compare the full ensemble, including the control and the 9 perturbed members:

In [88]:
# Calculate SPI median differences
spi_difference_site_ensemble = comparison_monthly_statistics(spi_era5drought_site_ensemble, spi_reproduced_site_ensemble)

# Display with style
display_monthly_statistics(spi_difference_site_ensemble)

In [89]:
# Calculate SPI median differences
spei_difference_site_ensemble = comparison_monthly_statistics(spei_era5drought_site_ensemble, spei_reproduced_site_ensemble)

# Display with style
display_monthly_statistics(spei_difference_site_ensemble)

These statistics are similar to those seen in the control member comparison as well as the reanalysis comparison,
as are the time series comparisons for SPI
(Figures {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_1>`–{numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_10>`;
compare Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries>`)
and SPEI
(Figures {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_1>`–{numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_10>`;
compare Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries>`).
As such, we can extend our conclusions on the reproducibility of ERA5–Drought from ERA5 to the entire ensemble dataset.

Notably,
some of the perturbed members are much spikier than the reanalysis
(e.g. SPI-1 for member 8; Figure {numref}`{number} <indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_8>`)
with extreme values of and changes in SPI / SPEI for short accumulation periods.
These spikes are generally well-reproduced.
For further analysis of the behaviour of the ensemble,
including the associated quality flags,
we refer the reader to
the quality assessments on the uncertainty in ERA5–Drought
linked in the _Key resources_ section at the bottom of this notebook.

In [90]:
for m in trange(1, 11):  # trange: range with tqdm progress bar
    plot_time_series_comparison_spi(spi_era5drought_site_ensemble.sel({ENSEMBLE_DIMENSION: m}),
                                    spi_reproduced_site_ensemble.sel({ENSEMBLE_DIMENSION: m}),
                                    title_suffix=f" at {label_site} (ensemble member {m})",
                                    glue_label=f"indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_{m}")

::::{tab-set}
:::{tab-item} Member 1
:sync: ensemble1
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_1
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_1"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 2
:sync: ensemble2
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_2
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_2"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 3
:sync: ensemble3
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_3
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_3"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 4
:sync: ensemble4
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_4
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_4"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 5
:sync: ensemble5
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_5
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_5"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 6
:sync: ensemble6
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_6
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_6"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 7
:sync: ensemble8
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_7
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_7"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 8
:sync: ensemble8
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_8
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_8"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 9
:sync: ensemble9
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_9
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_9"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 10
:sync: ensemble10
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_10
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spi-timeseries_ens_10"

SPI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
::::

In [91]:
for m in trange(1, 11):  # trange: range with tqdm progress bar
    plot_time_series_comparison_spei(spei_era5drought_site_ensemble.sel({ENSEMBLE_DIMENSION: m}),
                                     spei_reproduced_site_ensemble.sel({ENSEMBLE_DIMENSION: m}),
                                     title_suffix=f" at {label_site} (ensemble member {m})",
                                     glue_label=f"indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_{m}")

::::{tab-set}
:::{tab-item} Member 1
:sync: ensemble1
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_1
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_1"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 2
:sync: ensemble2
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_2
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_2"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 3
:sync: ensemble3
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_3
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_3"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 4
:sync: ensemble4
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_4
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_4"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 5
:sync: ensemble5
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_5
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_5"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 6
:sync: ensemble6
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_6
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_6"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 7
:sync: ensemble8
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_7
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_7"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 8
:sync: ensemble8
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_8
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_8"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 9
:sync: ensemble9
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_9
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_9"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
:::{tab-item} Member 10
:sync: ensemble10
```{glue:figure} indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_10
:name: "indicator_derived-drought-historical-monthly_consistency_q01_fig-spei-timeseries_ens_10"

SPEI time series downloaded from ERA5–Drought and reproduced from ERA5 precipitation data (left) and the difference between the two (right), for the example site of Addis Ababa, Ethiopia.
Colours in the left-hand column correspond to SPEI categories (e.g. "extremely dry") in [[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)].
This panel shows one member of the ensemble in either dataset.
```
:::
::::

(indicator_derived-drought-historical-monthly_consistency_q01:section-conclusion)=
### 6. Conclusions
In this notebook, we have assessed the reproducibility of drought indicators and associated quality flags in ERA5–Drought based on the underpinning ERA5 data.
A pipeline for reproducing SPI and SPEI from ERA5 data was set up and applied to both the main reanalysis and the ensemble.
Comparisons were made in one example site
(Addis Ababa in Ethiopia)
and the surrounding region
(Horn of Africa);
this notebook can easily be downloaded and adapted to a different area or time span of interest.

We can conclude that ERA5–Drought is highly reproducible.
For SPI, reproduced values were generally identical to values in ERA5–Drought,
with discrepancies taking the form of isolated spikes or occurring in areas that would be quality-masked anyway.
The same was true for the probability of zero precipitation (_p{sub}`0`_) quality flag,
which matched in ≥99% of match-ups.
Larger differences were seen in the SPI normality (_α_) quality flag (≥74% agreement)
for reasons that are not entirely clear
but likely related to zero-precipitation months that are captured by the _p{sub}`0`_ quality flag.
For SPEI,
differences were larger,
which may be explained by differences in the processing pipeline
such as the exact choice of general logistic distribution used,
but still small and unlikely to impact common use cases for drought classification and monitoring.
The SPEI normality (_α_) quality flag showed good agreement (≥87%),
especially considering the differences in the fitted distributions.

Users who intend to use ERA5–Drought can do so confidently.
The included quality flags can be used to filter out low-quality data.
Some of the effects seen in this notebook,
such as slight differences in fitted parameters,
are an inherent source of uncertainty in indicators like SPI and SPEI in any dataset.
The uncertainty in ERA5–Drought,
based on the included ensemble,
is explored in more detail in separate quality assessments linked in the next section.

## ℹ️ If you want to know more

### Key resources
The CDS catalogue entries for the data used were:
* Complete ERA5 global atmospheric reanalysis: [reanalysis-era5-complete](https://doi.org/10.24381/cds.143582cf)
* ERA5 hourly data on single levels from 1940 to present: [reanalysis-era5-single-levels](https://doi.org/10.24381/cds.adbb2d47)
* Monthly drought indices from 1940 to present derived from ERA5 reanalysis: [derived-drought-historical-monthly](https://doi.org/10.24381/9bea5e16)
  * **Reproducibility of drought indicators in the ERA5–Drought dataset**
  * [](./indicator_derived-drought-historical-monthly_uncertainty_q01)
  * [](./indicator_derived-drought-historical-monthly_uncertainty_q02)

Code libraries used:
* [earthkit](https://github.com/ecmwf/earthkit)
  * [earthkit-data](https://github.com/ecmwf/earthkit-data)
  * [earthkit-plots](https://github.com/ecmwf/earthkit-plots)
* [scipy.stats](https://docs.scipy.org/doc/scipy/reference/stats.html)

More about drought indicators:
* SPI: [The relationship of drought frequency and duration to time scales](https://climate.colostate.edu/pdfs/relationshipofdroughtfrequency.pdf)
* SPEI: [A Multiscalar Drought Index Sensitive to Global Warming: The Standardized Precipitation Evapotranspiration Index](https://doi.org/10.1175/2009JCLI2909.1)
* [Candidate Distributions for Climatological Drought Indices (SPI and SPEI)](https://doi.org/10.1002/joc.4267)
* [ERA5–Drought: Global drought indices based on ECMWF reanalysis](https://doi.org/10.1038/s41597-025-04896-y)
* [The European and Global Drought Observatories (EDO, GDO)](https://drought.emergency.copernicus.eu/)

More about ERA5:
* [The ERA5 global reanalysis](https://doi.org/10.1002/qj.3803)
* [The ERA5 global reanalysis from 1940 to 2022](https://doi.org/10.1002/qj.4803)
* [Ensemble of data assimilations at ECMWF](https://doi.org/10.21957/obke4k60)

### References

[[ECIU+25](https://eciu.net/analysis/reports/2025/estimated-financial-losses-faced-by-uk-farmers-due-dry-weather-impacts-on-key-arable-crops)] Energy & Climate Intelligence Unit, ‘Estimated financial losses faced by UK farmers due dry weather impacts on key arable crops’, Energy & Climate Intelligence Unit, London, United Kingdom, Dec. 2025.

[[EDO+25](https://drought.emergency.copernicus.eu/data/factsheets/factsheet_spi.pdf)] EDO – European Drought Observatory, ‘EDO and GDO indicator factsheet: _Standardized Precipitation Index (SPI)_’, Copernicus Emergency Management Service, Mar. 2025. Accessed: Feb. 09, 2026. [Online]. Available: https://drought.emergency.copernicus.eu/data/factsheets/factsheet_spi.pdf

[[Franch-Pardo+25](https://doi.org/10.48088/ejg.i.fra.16.2.286.297)] I. Franch-Pardo, P. A. F. Puig, and A. Cerdà, ‘Geospatial Technologies in Crisis Response: Analyzing the 2024 Floods in Valencia, Spain’, European Journal of Geography, vol. 16, no. 2, pp. 286–297, Aug. 2025, doi: 10.48088/ejg.i.fra.16.2.286.297.

[[Gebrechorkos+19](https://doi.org/10.1038/s41598-019-47933-8)] S. H. Gebrechorkos, S. Hülsmann, and C. Bernhofer, ‘Long-term trends in rainfall and temperature using high-resolution climate datasets in East Africa’, Sci Rep, vol. 9, no. 1, p. 11376, Aug. 2019, doi: 10.1038/s41598-019-47933-8.

[[Hersbach+20](https://doi.org/10.1002/qj.3803)] H. Hersbach et al., ‘The ERA5 global reanalysis’, Quarterly Journal of the Royal Meteorological Society, vol. 146, no. 730, pp. 1999–2049, May 2020, doi: 10.1002/qj.3803.

[[IPCC+23](https://doi.org/10.59327/IPCC/AR6-9789291691647)] IPCC, ‘Climate Change 2023: Synthesis Report. Contribution of Working Groups I, II and III to the Sixth Assessment Report of the Intergovernmental Panel on Climate Change’, Intergovernmental Panel on Climate Change (IPCC), Geneva, Switzerland, Jul. 2023. doi: 10.59327/IPCC/AR6-9789291691647.

[[Keune+25](https://doi.org/10.1038/s41597-025-04896-y)] J. Keune, F. Di Giuseppe, C. Barnard, E. Damasio da Costa, and F. Wetterhall, ‘ERA5–Drought: Global drought indices based on ECMWF reanalysis’, Scientific Data, vol. 12, p. 616, Apr. 2025, doi: 10.1038/s41597-025-04896-y.

[[McKee+93](https://climate.colostate.edu/pdfs/relationshipofdroughtfrequency.pdf)] T. B. McKee, N. J. Doesken, and J. Kleist, ‘The relationship of drought frequency and duration to time scales’, in Eighth Conference on Applied Climatology, Anaheim, California, USA, Jan. 1993.

[[Shapiro+65](https://doi.org/10.1093/biomet/52.3-4.591)] S. S. Shapiro and M. B. Wilk, ‘An analysis of variance test for normality (complete samples)’, Biometrika, vol. 52, no. 3–4, pp. 591–611, Dec. 1965, doi: 10.1093/biomet/52.3-4.591.

[[Soci+24](https://doi.org/10.1002/qj.4803)] C. Soci et al., ‘The ERA5 global reanalysis from 1940 to 2022’, Quarterly Journal of the Royal Meteorological Society, vol. 150, no. 764, pp. 4014–4048, Jul. 2024, doi: 10.1002/qj.4803.

[[Stagge+15](https://doi.org/10.1002/joc.4267)] J. H. Stagge, L. M. Tallaksen, L. Gudmundsson, A. F. Van Loon, and K. Stahl, ‘Candidate Distributions for Climatological Drought Indices (SPI and SPEI)’, International Journal of Climatology, vol. 35, no. 13, pp. 4027–4040, Feb. 2015, doi: 10.1002/joc.4267.

[[UNICEF+24](https://reliefweb.int/node/4111326)] UNICEF, ‘Latin America and Caribbean Region Flash Update No. 2 (Climate-related crisis in the Amazon Region)’, UNICEF, Nov. 2024.

[[Vicente-Serrano+10](https://doi.org/10.1175/2009JCLI2909.1)] S. M. Vicente-Serrano, S. Beguería, and J. I. López-Moreno, ‘A Multiscalar Drought Index Sensitive to Global Warming: The Standardized Precipitation Evapotranspiration Index’, Journal of Climate, vol. 23, no. 7, pp. 1696–1718, Apr. 2010, doi: 10.1175/2009JCLI2909.1.